## Official Denver Airbnb Data Analysis-Ready CTEs 

In [52]:
/* Official Denver Airbnb Data Analysis-Ready CTEs

- cleaned_listings v1 (frozen on Oct 1, 2026)
- cleaned_calendar v1 (frozen on Oct 1, 2026)
- cleaned_reviews v1 (frozen on Oct 1, 2026)

neighbourhoods.csv (keeping as a reference table)
- no cleaning CTE needed
- 1 neighbourhood is present in this dataset while not being present in the cleaned_listings snapshot - Sun Valley
- cleaned_listings.neighbourhood_cleansed serves as the primary geographic reference 
- neighbourhoods.csv is retained only as a reference for analyses requiring all defined neighborhoods, including those with zero listings.

*/

-- cleaned_listings

WITH base_listings AS (
	SELECT 
		id, last_scraped, source, name,
	
		host_id, host_name, host_location, 
		CASE 
			WHEN host_location IS NULL THEN 'No Location'
			WHEN LOWER(host_location) LIKE '%denver%' THEN 'Denver'
			WHEN TRIM(LOWER(host_location)) LIKE '%, co' OR LOWER(host_location) LIKE '%colorado%' THEN 'Other Colorado'
			WHEN TRIM(LOWER(host_location)) LIKE '%, __' OR LOWER(host_location) LIKE '%united states%' THEN 'Other US State'
			ELSE 'Other Country'
		END AS host_location_category, -- broader category for host_location 
	
		host_is_superhost, host_listings_count, calculated_host_listings_count, host_identity_verified,
		CASE
			WHEN calculated_host_listings_count = 1 THEN 'Single-listing host'
			WHEN calculated_host_listings_count BETWEEN 2 AND 4 THEN 'Small multi-listing host'
			WHEN calculated_host_listings_count BETWEEN 5 AND 9 THEN 'Medium operator'
			WHEN calculated_host_listings_count >= 10 THEN 'Large/professional operator'
		END AS host_scale, -- category column for calculated_host_listings_count ranges
	
		neighbourhood_cleansed, latitude, longitude,
	
		property_type, 
		CASE 
			WHEN property_type = 'Tiny home' THEN 'Specialty/Other'
			WHEN LOWER(property_type) LIKE '%home%' OR LOWER(property_type) LIKE '%bungalow%' OR LOWER(property_type) LIKE '%cottage%' THEN 'House/Home'
			WHEN LOWER(property_type) LIKE '%apartment%' OR LOWER(property_type) LIKE '%rental unit%' OR LOWER(property_type) LIKE '%loft%' THEN 'Apartment/Rental Unit'
			WHEN LOWER(property_type) LIKE '%condo%' THEN 'Condo'
			WHEN LOWER(property_type) LIKE '%townhouse%' THEN 'Townhouse'
			WHEN LOWER(property_type) LIKE '%guest%' THEN 'Guesthouse'
			WHEN LOWER(property_type) LIKE '%hotel%' OR LOWER(property_type) LIKE '%hostel%' OR LOWER(property_type) LIKE '%bed and breakfast%' THEN 'Hotel/Hospitality'
			WHEN LOWER(property_type) LIKE '%villa%' THEN 'Villa'
			ELSE 'Speciality/Other'
		END AS property_category, -- broader category for property_type
	
		room_type, accommodates, bedrooms, beds, amenities,
		 LEN(
			FROM_JSON(amenities, '["VARCHAR"]')
    	) AS amenity_count, -- converting amenities column to a list of VARCHAR values and counting amenities in the list for each listing

		bathrooms, bathrooms_text, 
		CASE 
			WHEN LOWER(bathrooms_text) LIKE '%private%' THEN 'Private'
			WHEN LOWER(bathrooms_text) LIKE '%shared%' THEN 'Shared'
			WHEN bathrooms_text IS NOT NULL THEN 'Standard'
			ELSE NULL
		END AS bathroom_type, -- categorizing the type of bathroom from bathrooms_text
	
		price,
		TRY_CAST(
            REPLACE(
                REPLACE(price, '$', ''),
                ',', ''
            ) AS DECIMAL(10,2)
        ) AS cleaned_price, -- converting VARCHAR price values to a usable numeric data type for calculations 
	
		minimum_nights, maximum_nights, has_availability, availability_30, availability_60, availability_90, availability_365, availability_eoy, estimated_occupancy_l365d,  estimated_revenue_l365d,
		CASE 
			WHEN minimum_nights <= 6 THEN 'Short stay'
			WHEN minimum_nights <= 27 THEN 'Medium Stay'
			WHEN minimum_nights <= 45 THEN 'Monthly stay'
			WHEN minimum_nights >= 46 THEN 'Extended stay'
		ELSE NULL
		END AS stay_policy, -- category column for minimum_nights ranges 
	
		first_review, last_review, number_of_reviews, number_of_reviews_ltm, number_of_reviews_l30d, number_of_reviews_ly,
		CASE 
			WHEN number_of_reviews_l30d >= 1 THEN 'Recently Reviewed'
			WHEN number_of_reviews_ltm >= 1 THEN 'Reviewed in Last Year'
			WHEN number_of_reviews >= 1 THEN 'Historically Reviewed'
			WHEN number_of_reviews = 0 THEN 'Never Reviewed'
		END AS listing_activity_status, -- category column for number_of_reviews_... fields
	
		review_scores_rating, review_scores_accuracy, review_scores_communication, review_scores_location, review_scores_value, reviews_per_month
FROM 'detailed_listings.csv'
),
	
room_type_price_quartiles AS (
	SELECT 
		room_type,
		QUANTILE_CONT(cleaned_price, 0.25) AS q1,
		QUANTILE_CONT(cleaned_price, 0.75) AS q3,
		QUANTILE_CONT(cleaned_price, 0.75) - QUANTILE_CONT(cleaned_price, 0.25) AS iqr
	FROM base_listings
	WHERE cleaned_price IS NOT NULL
	GROUP BY room_type
), -- intermediate CTE to calculate respective q1, q3, and iqr for each room_type

room_type_price_stats AS (
	SELECT 
		room_type,
		q1,
		q3,
		iqr,
		q1 - (1.5 * iqr) AS lower_bound,
		q3 + (1.5 * iqr) AS upper_bound
	FROM room_type_price_quartiles
), -- intermediate CTE to consolidate quartile values and calculated lower and upper bounds for each room_type

cleaned_listings AS (
	SELECT 
		b.*,
		CASE 
			WHEN b.cleaned_price IS NULL THEN 'Missing price'
			WHEN b.cleaned_price < p.lower_bound THEN 'Low price outlier'
			WHEN b.cleaned_price > p.upper_bound THEN 'High price outlier'
			ELSE 'Typical range' 
		END AS price_status -- category column for price, based on respective calculations for each room_type
	FROM base_listings AS b
	LEFT JOIN room_type_price_stats AS p
		ON b.room_type = p.room_type
), -- final cleaned_listings CTE

-- cleaned_calendar
	
cleaned_calendar AS (
	SELECT 
		c.listing_id,	
		CAST(c.date AS DATE) AS date,
		c.available,
		c.minimum_nights,
		c.maximum_nights,
		YEAR(c.date) AS year,
		MONTH(c.date) AS month,
		CAST(DATE_TRUNC('month', c.date) AS DATE) AS year_month
	FROM 'detailed_calendar.csv' AS c
	INNER JOIN cleaned_listings AS l
		ON c.listing_id = l.id
),

-- cleaned_reviews 

cleaned_reviews AS (
	SELECT 
		r.listing_id,
		r.id AS review_id,
		CAST(r.date AS DATE) AS date,
		r.reviewer_id,
		r.reviewer_name,
		r.comments,
		YEAR(r.date) AS year,
		MONTH(r.date) AS month,
		CAST(DATE_TRUNC('month', r.date) AS DATE) AS year_month
	FROM 'detailed_reviews.csv' AS r
	INNER JOIN cleaned_listings AS l
		ON r.listing_id = l.id
)

SELECT *
FROM cleaned_reviews;

,listing_id,review_id,date,reviewer_id,reviewer_name,comments,year,month,year_month
0,360,307152490,2018-08-13 00:00:00+00:00,46723582,Madeleine,"This space was perfect! Great location, hosts,...",2018,8,2018-08-01 00:00:00+00:00
1,360,311601388,2018-08-21 00:00:00+00:00,68751664,Janelle,Hidden Gem in Denver. Magical Secret garden ce...,2018,8,2018-08-01 00:00:00+00:00
2,360,312497032,2018-08-23 00:00:00+00:00,57773484,Ziad,Amazing stay at one of the best kept AirBnB se...,2018,8,2018-08-01 00:00:00+00:00
3,360,313089933,2018-08-24 00:00:00+00:00,11982181,Andrea,The cottage has a great setting with a garden ...,2018,8,2018-08-01 00:00:00+00:00
4,360,314492150,2018-08-26 00:00:00+00:00,14620568,Iris,"Super cute place, very peaceful (loved the gar...",2018,8,2018-08-01 00:00:00+00:00
...,...,...,...,...,...,...,...,...,...
354641,978569724187627478,1342993770589825512,2025-01-26 00:00:00+00:00,666272906,Eddy D,Mi estancia en este hogar fue simplemente exce...,2025,1,2025-01-01 00:00:00+00:00
354642,978569724187627478,1345841702307804371,2025-01-30 00:00:00+00:00,3698037,Meredith,The place is cute but not centrally located in...,2025,1,2025-01-01 00:00:00+00:00
354643,978569724187627478,1348009049967450566,2025-02-02 00:00:00+00:00,427361697,Madeleine Joy,Perfect home for a weekend trip!,2025,2,2025-02-01 00:00:00+00:00
354644,978569724187627478,1348719881413497182,2025-02-03 00:00:00+00:00,23943386,Michael,Great spot for our family as we traveled throu...,2025,2,2025-02-01 00:00:00+00:00


# Screenshots (Hidden to Save Space)

![image-11](image-11.png)


![image-12](image-12.png)


![image-13](image-13.png)


![image-14](image-14.png)


**Denver Airbnb Analysis - Project Notes (Analytical Data Preparation)**
- price: 4,939 listings → 4,251 populated prices → 688 missing prices → 0 failed conversions → strongly right-skewed price distribution → at least one extreme contextual outlier requiring special handling.
- host_listings_count is based on the host's Airbnb-reported listing count, whereas calculated_host_listings_count is calculated from listings found in the current scrape/geographic dataset.
- bathrooms is the clean numeric measure for calculations and modeling, while bathrooms_text preserves bathroom type. Later, we can derive something like bathroom_type (private, shared, standard) from the text and potentially drop the raw text field from the final modeled dataset.
- About 96% of listings have a unique overall amenities combination (4,743 / 4,939). So the complete amenities string is not a useful categorical dimension.
- host_location_category: The category describes the host's reported profile location. It does not establish host residency or where the property owner lives.
- Reviews relationship: detailed_reviews.listing_id links reviews to cleaned_listings.id. All 638 current listings without review records have number_of_reviews = 0, confirming that their absence from the reviews table is expected. The raw reviews dataset contains 95 reviews associated with 8 listing IDs outside the current 4,939-listing universe. These records are excluded from cleaned_reviews using an INNER JOIN to cleaned_listings.

## Price

In [2]:
SELECT 
	DISTINCT TYPEOF(price) AS price_data_type
FROM 'detailed_listings.csv';

,price_data_type
0,VARCHAR


In [4]:
SELECT price FROM 'detailed_listings.csv'
LIMIT 20;

,price
0,$106.35
1,$32.35
2,$80.00
3,$44.27
4,$191.72
5,$94.75
6,$101.66
7,$35.47
8,$102.71
9,$78.67


In [3]:
WITH price AS (
	SELECT 
		COUNT(*) AS total_values,
		COUNT(price) AS price_values,
		COUNT(CASE WHEN price IS NULL THEN 1 END) AS null_price_values
	FROM 'detailed_listings.csv'
)

SELECT *,
	ROUND(price_values/total_values * 100, 2) AS percentage_of_listings_with_price
FROM price;

,total_values,price_values,null_price_values,percentage_of_listings_with_price
0,4939,4251,688,86.07


In [10]:
/* Modifying the price column to be read as a number and able to be used in calculations */ 

SELECT 
	price,
	TRY_CAST (
		REPLACE(
			REPLACE(price, '$', ''),
			',',
			''
		)
		AS DECIMAL(10, 2)
	) AS cleaned_price
FROM 'detailed_listings.csv'
LIMIT 10;

,price,cleaned_price
0,$106.35,106.35
1,$32.35,32.35
2,$80.00,80.00
3,$44.27,44.27
4,$191.72,191.72
5,$94.75,94.75
6,$101.66,101.66
7,$35.47,35.47
8,$102.71,102.71
9,$78.67,78.67


In [11]:
/* Calculating min, max, avg, median, zero price values, and over xxx amounts for the cleaned prices */

WITH cleaned_prices AS (
	SELECT 
		TRY_CAST (
			REPLACE(
				REPLACE(price, '$', ''),
				',',
				''
			)
			AS DECIMAL(10, 2)
		) AS cleaned_price
	FROM 'detailed_listings.csv'
) 

SELECT 
	MIN(cleaned_price) AS min_price,
	MAX(cleaned_price) AS max_price,
	ROUND(AVG(cleaned_price), 2) AS avg_price,
	MEDIAN(cleaned_price) AS median_price,
	COUNT(CASE WHEN cleaned_price = 0 THEN 1 END) AS zero_price_values,
	COUNT(CASE WHEN cleaned_price > 500 AND cleaned_price < 1000 THEN 1 END) AS over_500_listings,
	COUNT(CASE WHEN cleaned_price > 1000 AND cleaned_price < 2000 THEN 1 END) AS over_1000_listings,
	COUNT(CASE WHEN cleaned_price > 2000 THEN 1 END) AS over_2000_listings
FROM cleaned_prices;

,min_price,max_price,avg_price,median_price,zero_price_values,over_500_listings,over_1000_listings,over_2000_listings
0,7.38,110616.6,276.04,176.45,0,336,53,9


In [12]:
/* Showing the top 20 most expensive listings */ 

WITH cleaned_prices AS (
	SELECT 
		id, 
		name,
		TRY_CAST (
			REPLACE(
				REPLACE(price, '$', ''),
				',',
				''
			)
			AS DECIMAL(10, 2)
		) AS cleaned_price,
		property_type, room_type, accommodates, bedrooms, bathrooms, minimum_nights, availability_365, number_of_reviews, neighbourhood_cleansed
	FROM 'detailed_listings.csv'
) 

SELECT *
FROM cleaned_prices
WHERE cleaned_price IS NOT NULL
ORDER BY cleaned_price DESC
LIMIT 20;

,id,name,cleaned_price,property_type,room_type,accommodates,bedrooms,bathrooms,minimum_nights,availability_365,number_of_reviews,neighbourhood_cleansed
0,21712656,Marion,110616.60,Entire condo,Entire home/apt,2,<NA>,NaN,30,31,21,Cheesman Park
1,35382615,Newly Redecorated! Central Park Family Favorite!,23573.00,Entire home,Entire home/apt,5,2,2.0,1,91,162,Stapleton
2,36515976,"The Ramble Hotel, Bunkhouse",9690.00,Room in boutique hotel,Private room,2,1,1.0,29,365,6,Five Points
3,687686195085166733,New Urban Oasis - with covered deck and worksp...,5877.50,Entire townhouse,Entire home/apt,12,3,3.0,2,365,45,Chaffee Park
4,45803041,Escape to Denver King stile,3526.60,Private room in rental unit,Private room,2,<NA>,1.0,29,270,1,East Colfax
5,1195056124079372458,The Castle Marne,2995.00,Castle,Entire home/apt,10,5,8.0,1,295,2,City Park West
6,28057388,Huge Denver Townhouse with 4 Bedrooms + Office,2941.50,Entire townhouse,Entire home/apt,9,4,3.5,2,85,132,Skyland
7,655281960656437689,New build house with heated pool!,2373.67,Entire home,Entire home/apt,12,6,6.0,1,319,46,Belcaro
8,583955778204351946,Historic Charm - Downtown Denver Gem,2116.00,Entire home,Entire home/apt,16,5,5.0,2,319,39,Cheesman Park
9,1062497121327188829,Downtown's Largest Rental - Walk to Everything!,1988.62,Entire condo,Entire home/apt,16,8,4.0,1,344,12,Five Points


In [15]:
WITH cleaned_prices AS (
	SELECT 
		property_type,
		room_type,
		accommodates,
		bedrooms,
		bathrooms,
		minimum_nights,
		neighbourhood_cleansed,
		TRY_CAST (
				REPLACE(
					REPLACE(price, '$', ''),
					',',
					''
				)
				AS DECIMAL(10, 2)
			) AS cleaned_price
	FROM 'detailed_listings.csv'
)

SELECT * 
FROM cleaned_prices
WHERE property_type = 'Entire condo' AND accommodates = 2
ORDER BY cleaned_price DESC;

-- $110,616.60 vs. roughly $200–$400 for many comparable listings

,property_type,room_type,accommodates,bedrooms,bathrooms,minimum_nights,neighbourhood_cleansed,cleaned_price
0,Entire condo,Entire home/apt,2,<NA>,NaN,30,Cheesman Park,110616.60
1,Entire condo,Entire home/apt,2,1,NaN,1,Highland,385.90
2,Entire condo,Entire home/apt,2,<NA>,1.0,1,Five Points,360.00
3,Entire condo,Entire home/apt,2,1,1.0,1,Highland,353.00
4,Entire condo,Entire home/apt,2,1,1.0,1,Highland,340.91
...,...,...,...,...,...,...,...,...
198,Entire condo,Entire home/apt,2,1,NaN,30,Union Station,NaN
199,Entire condo,Entire home/apt,2,1,NaN,30,Union Station,NaN
200,Entire condo,Entire home/apt,2,<NA>,1.0,30,CBD,NaN
201,Entire condo,Entire home/apt,2,1,1.0,29,Union Station,NaN


In [13]:
WITH cleaned_prices AS (
    SELECT
        price,
        TRY_CAST(
            REPLACE(
                REPLACE(price, '$', ''),
                ',', ''
            ) AS DECIMAL(10,2)
        ) AS cleaned_price
    FROM 'detailed_listings.csv'
)

SELECT
    COUNT(*) AS failed_conversions
FROM cleaned_prices
WHERE price IS NOT NULL
  AND cleaned_price IS NULL;

,failed_conversions
0,0


## Analysis-Ready Listings Table

In [10]:
SELECT 
	id,
	last_scraped,
	source,
	name,
	host_id,
	host_name,
	host_location,
	host_is_superhost,
	host_listings_count,
	host_identity_verified,
	neighbourhood_cleansed,
	latitude,
	longitude,
	property_type,
	room_type,
	accommodates,
	bathrooms,
	bathrooms_text,
	bedrooms,
	beds,
	amenities,
	price,
	minimum_nights,
	maximum_nights,
	has_availability,
	availability_30,
	availability_60,
	availability_90,
	availability_365,
	number_of_reviews,
	number_of_reviews_ltm,
	number_of_reviews_l30d,
	availability_eoy,
	number_of_reviews_ly,
	estimated_occupancy_l365d,
	estimated_revenue_l365d,
	first_review,
	last_review,
	review_scores_rating,
	review_scores_accuracy,
	review_scores_communication,
	review_scores_location,
	review_scores_value,
	calculated_host_listings_count,
	reviews_per_month
FROM 'detailed_listings.csv';

,id,last_scraped,source,name,host_id,host_name,host_location,host_is_superhost,host_listings_count,host_identity_verified,neighbourhood_cleansed,latitude,longitude,property_type,room_type,accommodates,bathrooms,bathrooms_text,bedrooms,beds,amenities,price,minimum_nights,maximum_nights,has_availability,availability_30,availability_60,availability_90,availability_365,number_of_reviews,number_of_reviews_ltm,number_of_reviews_l30d,availability_eoy,number_of_reviews_ly,estimated_occupancy_l365d,estimated_revenue_l365d,first_review,last_review,review_scores_rating,review_scores_accuracy,review_scores_communication,review_scores_location,review_scores_value,calculated_host_listings_count,reviews_per_month
0,360,2026-06-30 00:00:00+00:00,city scrape,Denver’s Peaceful Oasis for Travel Nurses & No...,666,Jennifer & Gio,"Denver, CO",True,2,True,Highland,39.766415,-105.002098,Entire guesthouse,Entire home/apt,2,1.0,1 bath,2,2,"[""Shared hot tub"", ""Wifi \u2013 36 Mbps"", ""Cen...",$106.35,29,364,True,0,27,57,332,186,1,0,152,3,58,6168,2018-08-13 00:00:00+00:00,2025-08-18 00:00:00+00:00,4.98,4.97,4.99,4.98,4.90,1,1.94
1,364,2026-07-02 00:00:00+00:00,previous scrape,Lodo / RiNo LOFT via airport train,783,Jason,"Mesa, AZ",False,1,True,Five Points,39.766720,-104.979060,Entire loft,Entire home/apt,3,NaN,1.5 baths,1,<NA>,"[""Indoor fireplace"", ""Carbon monoxide alarm"", ...",$32.35,185,365,True,23,53,83,358,87,0,0,176,0,0,0,2009-05-18 00:00:00+00:00,2016-04-26 00:00:00+00:00,4.85,4.78,4.96,4.65,4.71,1,0.42
2,592,2026-06-30 00:00:00+00:00,city scrape,private,933,Jill,"Denver, CO",True,1,True,North Park Hill,39.754810,-104.911060,Private room in home,Private room,2,1.0,1 shared bath,<NA>,1,"[""Free parking on premises"", ""Dishwasher"", ""Pr...",$80.00,2,365,True,18,30,41,221,221,29,0,136,32,203,16240,2009-02-21 00:00:00+00:00,2026-05-30 00:00:00+00:00,4.90,4.81,4.96,4.84,4.88,1,1.05
3,686,2026-06-30 00:00:00+00:00,city scrape,Alexandra's Queen Bed Room Long-term Rental Only,990,Alexandra,"Denver, CO",False,1,True,North Capitol Hill,39.746950,-104.978380,Private room in home,Private room,1,1.0,1 private bath,<NA>,2,"[""Dishwasher"", ""Mini fridge"", ""Dishes and silv...",$44.27,30,120,True,6,28,58,148,252,0,0,148,2,0,0,2008-08-28 00:00:00+00:00,2025-05-14 00:00:00+00:00,4.77,4.75,4.91,4.87,4.82,1,1.16
4,1940,2026-06-30 00:00:00+00:00,city scrape,"Baker Studio Pet-friendly, Walkable, Patio",2150,Joanne,"Denver, CO",True,2,True,Baker,39.720205,-104.997499,Entire guesthouse,Entire home/apt,2,1.0,1 bath,<NA>,1,"[""Dishwasher"", ""Central air conditioning"", ""Di...",$191.72,1,1125,True,6,28,58,328,278,45,4,153,43,255,48889,2017-01-24 00:00:00+00:00,2026-06-26 00:00:00+00:00,4.97,4.96,4.99,4.90,4.90,2,2.42
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
4934,1715526172204650370,2026-06-30 00:00:00+00:00,city scrape,Sloan’s Sweet Spot: 2BR Hideaway Near the Lake,569123788,SkyRun Denver,"Denver, CO",True,24,True,West Colfax,39.739154,-105.042481,Entire home,Entire home/apt,4,1.0,1 bath,2,2,"[""Free parking on premises"", ""Dishes and silve...",$135.85,30,365,True,0,27,57,332,0,0,0,152,0,0,0,NaT,NaT,NaN,NaN,NaN,NaN,NaN,14,NaN
4935,1717154473335873479,2026-06-30 00:00:00+00:00,city scrape,New Modern Studio | Private Patio near Sloan's,1717154169106481664,Paola,None,False,1,True,Villa Park,39.733050,-105.050350,Entire guest suite,Entire home/apt,2,1.0,1 bath,1,1,"[""Central heating"", ""Dishwasher"", ""Portable he...",$126.50,2,1125,True,22,49,79,354,0,0,0,174,0,0,0,NaT,NaT,NaN,NaN,NaN,NaN,NaN,1,NaN
4936,1717653619123712424,2026-06-30 00:00:00+00:00,city scrape,Dual-Living City Park Bungalow - City & Mtn Views,22055594,Mike,"Denver, CO",True,3,True,Skyland,39.758946,-104.955208,Entire home,Entire home/apt,6,2.5,2.5 baths,2,3,"[""Free parking on premises"", ""Dedicated worksp...",$425.89,1,10,True,13,37,67,157,0,0,0,157,0,

In [9]:
SELECT 
	host_since,
 	host_response_time,
	host_response_rate,
	host_acceptance_rate,
	host_total_listings_count,
	instant_bookable
FROM 'detailed_listings.csv'
WHERE host_since IS NOT NULL 
	OR host_response_time IS NOT NULL 
	OR host_response_rate IS NOT NULL
	OR host_acceptance_rate IS NOT NULL
	OR host_total_listings_count IS NOT NULL
	OR instant_bookable IS NOT NULL;

,host_since,host_response_time,host_response_rate,host_acceptance_rate,host_total_listings_count,instant_bookable


In [12]:
SELECT 
	host_is_superhost,
	COUNT(*) AS superhost_count
FROM 'detailed_listings.csv'
GROUP BY host_is_superhost;

,host_is_superhost,superhost_count
0,False,2239
1,True,2700


In [13]:
SELECT 
	host_identity_verified,
	COUNT(*) AS host_identity_verified_count
FROM 'detailed_listings.csv'
GROUP BY host_identity_verified;

,host_identity_verified,host_identity_verified_count
0,False,85
1,True,4854


In [15]:
SELECT 
	SUM(CASE WHEN host_listings_count != calculated_host_listings_count THEN 1 ELSE 0 END) AS different_host_listings_counts,
	SUM(CASE WHEN host_listings_count = calculated_host_listings_count THEN 1 ELSE 0 END) AS same_host_listings_counts,
	SUM(CASE WHEN host_listings_count IS NULL THEN 1 ELSE 0 END) AS null_host_listings_count,
	SUM(CASE WHEN calculated_host_listings_count IS NULL THEN 1 ELSE 0 END) AS null_calculated_host_listings_count,
	COUNT(*) AS total_rows
FROM 'detailed_listings.csv';

,different_host_listings_counts,same_host_listings_counts,null_host_listings_count,null_calculated_host_listings_count,total_rows
0,1693.0,3246.0,0.0,0.0,4939


In [20]:
SELECT 
	DISTINCT host_id,
	host_listings_count,
	calculated_host_listings_count,
	ABS(host_listings_count - calculated_host_listings_count) AS count_difference
FROM 'detailed_listings.csv'
WHERE host_listings_count != calculated_host_listings_count
ORDER BY count_difference DESC;

,host_id,host_listings_count,calculated_host_listings_count,count_difference
0,263502162,1682,23,1659
1,121718072,810,69,741
2,126644161,720,1,719
3,509915863,489,1,488
4,13794009,322,1,321
...,...,...,...,...
781,43027364,2,1,1
782,1388894,2,1,1
783,6430080,2,1,1
784,160494969,3,2,1


In [19]:
SELECT 
	MIN(host_listings_count) AS min_host_listings_count,
	MEDIAN(host_listings_count) AS median_host_listings_count,
	MAX(host_listings_count) AS max_host_listings_count,
	MIN(calculated_host_listings_count) AS min_calculated_host_listings_count,
	MEDIAN(calculated_host_listings_count) AS median_calculated_host_listings_count,
	MAX(calculated_host_listings_count) AS max_calculated_host_listings_count
FROM 'detailed_listings.csv';

,min_host_listings_count,median_host_listings_count,max_host_listings_count,min_calculated_host_listings_count,median_calculated_host_listings_count,max_calculated_host_listings_count
0,1,2.0,1682,1,1.0,69


In [4]:
WITH calendar_available AS (
	SELECT 
		listing_id,
		COUNT(available) AS available
	FROM 'detailed_calendar.csv'
	WHERE available IS TRUE
	GROUP BY listing_id
)

SELECT 
	l.id,
	l.estimated_occupancy_l365d,
	c.available
FROM 'detailed_listings.csv' AS l
LEFT JOIN calendar_available AS c
	ON l.id = c.listing_id
	AND l.estimated_occupancy_l365d = c.available
WHERE c.available IS NOT NULL;

,id,estimated_occupancy_l365d,available
0,1311993,60,60
1,1493671313028071571,60,60
2,1392390355598665134,147,147
3,1529139049032823063,120,120
4,1289339166832347992,255,255
5,993532094378606945,232,232
6,49139097,174,174
7,1142772427149249407,120,120


## amenities exploration

In [58]:
SELECT 
	DISTINCT amenities
FROM 'detailed_listings.csv'
ORDER BY amenities
LIMIT 20;

,amenities
0,"["" Luxury Brands shampoo"", ""Central heating"",..."
1,"[""24 inch HDTV"", ""Free residential garage on p..."
2,"[""365 unscented conditioner"", ""Dr Bronners Pep..."
3,"[""37 inch HDTV with Apple TV"", ""Mini fridge"", ..."
4,"[""42 inch HDTV with Roku, Netflix, standard ca..."
5,"[""43 inch HDTV with Hulu, Netflix, Amazon Prim..."
6,"[""43 inch HDTV with premium cable, Roku"", ""Out..."
7,"[""47 inch HDTV with Apple TV, standard cable"",..."
8,"[""48 inch TV with Amazon Prime Video, Fire TV,..."
9,"[""50 inch HDTV with Amazon Prime Video, HBO Ma..."


In [60]:
SELECT 
	DISTINCT TYPEOF(amenities) AS amenities_data_type
FROM 'detailed_listings.csv';

,amenities_data_type
0,VARCHAR


In [59]:
SELECT 
	SUM(CASE WHEN amenities IS NULL THEN 1 ELSE 0 END) AS null_amenities,
	SUM(CASE WHEN amenities = '[]' THEN 1 ELSE 0 END) AS empty_list,
	COUNT(amenities) AS non_null_amenities,
	COUNT(*) AS total_rows,
	COUNT(DISTINCT amenities) AS distinct_amentities
FROM 'detailed_listings.csv';

,null_amenities,empty_list,non_null_amenities,total_rows,distinct_amentities
0,0.0,4.0,4939,4939,4743


In [61]:
SELECT 
	amenities,
	COUNT(*) AS count_of_listings
FROM 'detailed_listings.csv'
GROUP BY amenities
HAVING COUNT(*) >= 2
ORDER BY count_of_listings DESC;

,amenities,count_of_listings
0,"[""Dishwasher"", ""Exercise equipment"", ""Dishes a...",24
1,"[""Dishwasher"", ""Dishes and silverware"", ""Eleva...",13
2,"[""Dishwasher"", ""Dishes and silverware"", ""Eleva...",12
3,"[""Dishwasher"", ""Dishes and silverware"", ""Eleva...",11
4,"[""Free parking on premises"", ""Central heating""...",7
...,...,...
77,"[""Dishwasher"", ""Dishes and silverware"", ""Eleva...",2
78,"[""Portable heater"", ""Refrigerator"", ""Hair drye...",2
79,"[""Free parking on premises"", ""Dishwasher"", ""Hi...",2
80,"[""Free parking on premises"", ""Dishwasher"", ""Di...",2


In [63]:
SELECT
    id,
    amenities,
    FROM_JSON(amenities, '["VARCHAR"]') AS amenities_list
FROM 'detailed_listings.csv'
LIMIT 10;

,id,amenities,amenities_list
0,360,"[""Shared hot tub"", ""Wifi \u2013 36 Mbps"", ""Cen...","[Shared hot tub, Wifi – 36 Mbps, Central air c..."
1,364,"[""Indoor fireplace"", ""Carbon monoxide alarm"", ...","[Indoor fireplace, Carbon monoxide alarm, Fire..."
2,592,"[""Free parking on premises"", ""Dishwasher"", ""Pr...","[Free parking on premises, Dishwasher, Private..."
3,686,"[""Dishwasher"", ""Mini fridge"", ""Dishes and silv...","[Dishwasher, Mini fridge, Dishes and silverwar..."
4,1940,"[""Dishwasher"", ""Central air conditioning"", ""Di...","[Dishwasher, Central air conditioning, Dishes ..."
5,31503,"[""Dishes and silverware"", ""Wine glasses"", ""Pri...","[Dishes and silverware, Wine glasses, Private ..."
6,154999,"[""Free dryer \u2013 In building"", ""Central hea...","[Free dryer – In building, Central heating, Di..."
7,192430,"[""Free parking on premises"", ""Mountain view"", ...","[Free parking on premises, Mountain view, Port..."
8,370209,"[""Free parking on premises"", ""Coffee maker: fr...","[Free parking on premises, Coffee maker: frenc..."
9,477016,"[""Dishwasher"", ""Dishes and silverware"", ""Wine ...","[Dishwasher, Dishes and silverware, Wine glass..."


In [64]:
SELECT
    TYPEOF(
        FROM_JSON(amenities, '["VARCHAR"]')
    ) AS amenities_data_type
FROM 'detailed_listings.csv'
LIMIT 1;

,amenities_data_type
0,VARCHAR[]


In [68]:
WITH amenity_unnest AS (
	SELECT
	    id,
	    UNNEST(
	        FROM_JSON(amenities, '["VARCHAR"]')
	    ) AS amenity
	FROM 'detailed_listings.csv'
)

SELECT 
	amenity,
	COUNT(DISTINCT id) AS listings
FROM amenity_unnest
GROUP BY amenity
ORDER BY listings DESC
LIMIT 20;

,amenity,listings
0,Smoke alarm,4895
1,Carbon monoxide alarm,4727
2,Kitchen,4403
3,Hot water,4341
4,Wifi,4314
5,Fire extinguisher,4311
6,Dishes and silverware,4096
7,Microwave,4026
8,Hangers,4017
9,Bed linens,3996


In [67]:
SELECT
    amenity,
    COUNT(DISTINCT id) AS listings
FROM (
    SELECT
        id,
        UNNEST(FROM_JSON(amenities, '["VARCHAR"]')) AS amenity
    FROM 'detailed_listings.csv'
) t
GROUP BY amenity
ORDER BY listings DESC
LIMIT 20;

,amenity,listings
0,Smoke alarm,4895
1,Carbon monoxide alarm,4727
2,Kitchen,4403
3,Hot water,4341
4,Wifi,4314
5,Fire extinguisher,4311
6,Dishes and silverware,4096
7,Microwave,4026
8,Hangers,4017
9,Bed linens,3996


## cleaned_listings CTE (hidden to save space)

In [22]:
/* official cleaned_listings CTE 
v1 frozen as of 10-01-2026 */

WITH base_listings AS (
	SELECT 
		id, last_scraped, source, name,
	
		host_id, host_name, host_location, 
		CASE 
			WHEN host_location IS NULL THEN 'No Location'
			WHEN LOWER(host_location) LIKE '%denver%' THEN 'Denver'
			WHEN TRIM(LOWER(host_location)) LIKE '%, co' OR LOWER(host_location) LIKE '%colorado%' THEN 'Other Colorado'
			WHEN TRIM(LOWER(host_location)) LIKE '%, __' OR LOWER(host_location) LIKE '%united states%' THEN 'Other US State'
			ELSE 'Other Country'
		END AS host_location_category,
	
		host_is_superhost, host_listings_count, calculated_host_listings_count, host_identity_verified,
		CASE
			WHEN calculated_host_listings_count = 1 THEN 'Single-listing host'
			WHEN calculated_host_listings_count BETWEEN 2 AND 4 THEN 'Small multi-listing host'
			WHEN calculated_host_listings_count BETWEEN 5 AND 9 THEN 'Medium operator'
			WHEN calculated_host_listings_count >= 10 THEN 'Large/professional operator'
		END AS host_scale,
	
		neighbourhood_cleansed, latitude, longitude,
	
		property_type, 
		CASE 
			WHEN property_type = 'Tiny home' THEN 'Specialty/Other'
			WHEN LOWER(property_type) LIKE '%home%' OR LOWER(property_type) LIKE '%bungalow%' OR LOWER(property_type) LIKE '%cottage%' THEN 'House/Home'
			WHEN LOWER(property_type) LIKE '%apartment%' OR LOWER(property_type) LIKE '%rental unit%' OR LOWER(property_type) LIKE '%loft%' THEN 'Apartment/Rental Unit'
			WHEN LOWER(property_type) LIKE '%condo%' THEN 'Condo'
			WHEN LOWER(property_type) LIKE '%townhouse%' THEN 'Townhouse'
			WHEN LOWER(property_type) LIKE '%guest%' THEN 'Guesthouse'
			WHEN LOWER(property_type) LIKE '%hotel%' OR LOWER(property_type) LIKE '%hostel%' OR LOWER(property_type) LIKE '%bed and breakfast%' THEN 'Hotel/Hospitality'
			WHEN LOWER(property_type) LIKE '%villa%' THEN 'Villa'
			ELSE 'Speciality/Other'
		END AS property_category,
	
		room_type, accommodates, bedrooms, beds, amenities,
		 LEN(
			FROM_JSON(amenities, '["VARCHAR"]')
    	) AS amenity_count,

		bathrooms, bathrooms_text, 
		CASE 
			WHEN LOWER(bathrooms_text) LIKE '%private%' THEN 'Private'
			WHEN LOWER(bathrooms_text) LIKE '%shared%' THEN 'Shared'
			WHEN bathrooms_text IS NOT NULL THEN 'Standard'
			ELSE NULL
		END AS bathroom_type,
	
		price,
		TRY_CAST(
            REPLACE(
                REPLACE(price, '$', ''),
                ',', ''
            ) AS DECIMAL(10,2)
        ) AS cleaned_price,
	
		minimum_nights, maximum_nights, has_availability, availability_30, availability_60, availability_90, availability_365, availability_eoy, estimated_occupancy_l365d,  estimated_revenue_l365d,
		CASE 
			WHEN minimum_nights <= 6 THEN 'Short stay'
			WHEN minimum_nights <= 27 THEN 'Medium Stay'
			WHEN minimum_nights <= 45 THEN 'Monthly stay'
			WHEN minimum_nights >= 46 THEN 'Extended stay'
		ELSE NULL
		END AS stay_policy,
	
		first_review, last_review, number_of_reviews, number_of_reviews_ltm, number_of_reviews_l30d, number_of_reviews_ly,
		CASE 
			WHEN number_of_reviews_l30d >= 1 THEN 'Recently Reviewed'
			WHEN number_of_reviews_ltm >= 1 THEN 'Reviewed in Last Year'
			WHEN number_of_reviews >= 1 THEN 'Historically Reviewed'
			WHEN number_of_reviews = 0 THEN 'Never Reviewed'
		END AS listing_activity_status,
	
		review_scores_rating, review_scores_accuracy, review_scores_communication, review_scores_location, review_scores_value, reviews_per_month
FROM 'detailed_listings.csv'
),

room_type_price_quartiles AS (
	SELECT 
		room_type,
		QUANTILE_CONT(cleaned_price, 0.25) AS q1,
		QUANTILE_CONT(cleaned_price, 0.75) AS q3,
		QUANTILE_CONT(cleaned_price, 0.75) - QUANTILE_CONT(cleaned_price, 0.25) AS iqr
	FROM base_listings
	WHERE cleaned_price IS NOT NULL
	GROUP BY room_type
),

room_type_price_stats AS (
	SELECT 
		room_type,
		q1,
		q3,
		iqr,
		q1 - (1.5 * iqr) AS lower_bound,
		q3 + (1.5 * iqr) AS upper_bound
	FROM room_type_price_quartiles
),

cleaned_listings AS (
	SELECT 
		b.*,
		CASE 
			WHEN b.cleaned_price IS NULL THEN 'Missing price'
			WHEN b.cleaned_price < p.lower_bound THEN 'Low price outlier'
			WHEN b.cleaned_price > p.upper_bound THEN 'High price outlier'
			ELSE 'Typical range'
		END AS price_status
	FROM base_listings AS b
	LEFT JOIN room_type_price_stats AS p
		ON b.room_type = p.room_type
)

SELECT *
FROM cleaned_listings;

,id,last_scraped,source,name,host_id,host_name,host_location,host_location_category,host_is_superhost,host_listings_count,calculated_host_listings_count,host_identity_verified,host_scale,neighbourhood_cleansed,latitude,longitude,property_type,property_category,room_type,accommodates,bedrooms,beds,amenities,amenity_count,bathrooms,bathrooms_text,bathroom_type,price,cleaned_price,minimum_nights,maximum_nights,has_availability,availability_30,availability_60,availability_90,availability_365,availability_eoy,estimated_occupancy_l365d,estimated_revenue_l365d,stay_policy,first_review,last_review,number_of_reviews,number_of_reviews_ltm,number_of_reviews_l30d,number_of_reviews_ly,listing_activity_status,review_scores_rating,review_scores_accuracy,review_scores_communication,review_scores_location,review_scores_value,reviews_per_month,price_status
0,1609550371032300730,2026-06-30 00:00:00+00:00,city scrape,"Aspen Villa @ 3bedroom spacious, 10mls to DIA",503623356,Aderonke,None,No Location,True,4,4,True,Small multi-listing host,Montbello,39.780181,-104.828956,Entire home,House/Home,Entire home/apt,6,3,3,"[""Free parking on premises"", ""Dishwasher"", ""Di...",48,2.5,2.5 baths,Standard,$325.50,325.50,2,200,True,6,25,49,291,126,49,15950,Short stay,2026-03-20 00:00:00+00:00,2026-06-01 00:00:00+00:00,7,7,1,0,Recently Reviewed,4.86,4.86,5.00,5.00,5.00,2.04,Typical range
1,1610255566922845326,2026-06-30 00:00:00+00:00,city scrape,Historic Highlands Bungalow,176835061,Jordan,"Denver, CO",Denver,False,1,1,True,Single-listing host,West Highland,39.760630,-105.029790,Entire home,House/Home,Entire home/apt,4,1,1,"[""Free parking on premises"", ""Dedicated worksp...",15,1.0,1 bath,Standard,$249.00,249.00,2,3,True,9,27,52,138,138,21,5229,Short stay,2026-03-20 00:00:00+00:00,2026-05-31 00:00:00+00:00,3,3,1,0,Recently Reviewed,5.00,5.00,5.00,5.00,5.00,0.87,Typical range
2,1611181276254799867,2026-06-30 00:00:00+00:00,city scrape,Luxury Downtown Condo with Larimer Square Views,114068121,My Sweet Rentals,"Denver, CO",Denver,True,17,2,True,Small multi-listing host,Union Station,39.747480,-104.998500,Entire home,House/Home,Entire home/apt,5,3,3,"[""Free parking on premises"", ""Dedicated worksp...",11,NaN,3 baths,Standard,$360.10,360.10,30,365,True,11,41,71,251,166,0,0,Monthly stay,NaT,NaT,0,0,0,0,Never Reviewed,NaN,NaN,NaN,NaN,NaN,NaN,Typical range
3,1611820732712003794,2026-07-02 00:00:00+00:00,previous scrape,Luxury Downtown Living,670869345,Travis,"Denver, CO",Denver,False,1,1,True,Single-listing host,CBD,39.744766,-104.995472,Entire rental unit,Apartment/Rental Unit,Entire home/apt,2,1,<NA>,"[""Dishwasher"", ""Outdoor furniture"", ""Fire pit""...",45,NaN,1 bath,Standard,None,NaN,29,365,<NA>,0,0,0,34,0,0,<NA>,Monthly stay,NaT,NaT,0,0,0,0,Never Reviewed,NaN,NaN,NaN,NaN,NaN,NaN,Missing price
4,1612605935579140935,2026-06-30 00:00:00+00:00,city scrape,Cozy Stylish Apartment,341810603,Megan,"Denver, CO",Denver,False,1,1,True,Single-listing host,Speer,39.717530,-104.982040,Entire rental unit,Apartment/Rental Unit,Entire home/apt,2,1,1,"[""Free parking on premises"", ""Dishwasher"", ""Di...",38,1.0,1 bath,Standard,$64.90,64.90,30,365,True,0,15,45,320,140,0,0,Monthly stay,NaT,NaT,0,0,0,0,Never Reviewed,NaN,NaN,NaN,NaN,NaN,NaN,Typical range
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
4934,666032463912158546,2026-06-30 00:00:00+00:00,city scrape,New! Bright Denver Apartment 15minTODenver Air...,468233877,Nigatu,None,No Location,True,1,1,True,Single-listing host,Gateway - Green Valley Ranch,39.772230,-104.752220,Entire condo,Condo,Entire home/apt,5,2,3,"[""Free parking on premises"", ""Central heating""...",32,1.0,1 bath,Standard,$94.33,94.33,29,365,True,0,9,39,314,134,174,16413,Monthly stay,2022-10-14 00:00:00+00:00,2026-02-14 00:00:00+00:00,26,3,0,3,Reviewed in Last Year,4.73,4.73,4.92,

In [7]:
SELECT 
	DISTINCT host_location
FROM 'detailed_listings.csv'
WHERE LOWER(host_location) NOT LIKE '%, co%' AND LOWER(host_location) NOT LIKE '%colorado%' AND LOWER(host_location) LIKE '%, __';

,host_location
0,"New York, NY"
1,"Scottsdale, AZ"
2,"South Kingstown, RI"
3,"Rancho Mirage, CA"
4,"Tallahassee, FL"
...,...
99,"Ankeny, IA"
100,"Oklahoma City, OK"
101,"Edmond, OK"
102,"Midland, MI"


In [18]:
SELECT 
	minimum_nights,
	COUNT(*) AS occurrences
FROM 'detailed_listings.csv'
GROUP BY minimum_nights
ORDER BY minimum_nights;

,minimum_nights,occurrences
0,1,1337
1,2,857
2,3,204
3,4,38
4,5,17
5,6,4
6,7,20
7,9,1
8,10,1
9,14,5


In [52]:
WITH cleaned_listings AS (
	SELECT 
		id, last_scraped, source, name,
	
		host_id, host_name, host_location, host_is_superhost, host_listings_count, calculated_host_listings_count, host_identity_verified,
		CASE
			WHEN calculated_host_listings_count = 1 THEN 'Single-listing host'
			WHEN calculated_host_listings_count BETWEEN 2 AND 4 THEN 'Small multi-listing host'
			WHEN calculated_host_listings_count BETWEEN 5 AND 9 THEN 'Medium operator'
			WHEN calculated_host_listings_count >= 10 THEN 'Large/professional operator'
		END AS host_scale,
	
		neighbourhood_cleansed, latitude, longitude,
	
		property_type, room_type, accommodates, bedrooms, beds, amenities,
	
		bathrooms, bathrooms_text, 
		CASE 
			WHEN LOWER(bathrooms_text) LIKE '%private%' THEN 'Private'
			WHEN LOWER(bathrooms_text) LIKE '%shared%' THEN 'Shared'
			WHEN bathrooms_text IS NOT NULL THEN 'Standard'
			ELSE NULL
		END AS bathroom_type,
	
		price,
		TRY_CAST(
            REPLACE(
                REPLACE(price, '$', ''),
                ',', ''
            ) AS DECIMAL(10,2)
        ) AS cleaned_price,
	
		minimum_nights, maximum_nights, has_availability, availability_30, availability_60, availability_90, availability_365, availability_eoy, estimated_occupancy_l365d,  estimated_revenue_l365d,
	
		first_review, last_review, number_of_reviews, number_of_reviews_ltm, number_of_reviews_l30d, number_of_reviews_ly,
		CASE 
			WHEN number_of_reviews_l30d >= 1 THEN 'Recently Reviewed'
			WHEN number_of_reviews_ltm >= 1 THEN 'Reviewed in Last Year'
			WHEN number_of_reviews >= 1 THEN 'Historically Reviewed'
			WHEN number_of_reviews = 0 THEN 'Never Reviewed'
		END AS listing_activity_status,
	
		review_scores_rating, review_scores_accuracy, review_scores_communication, review_scores_location, review_scores_value, reviews_per_month
FROM 'detailed_listings.csv'
),

host_scale_count AS (
	SELECT 
		host_scale,
		COUNT(DISTINCT host_id) AS hosts,
		COUNT(*) AS listings
	FROM cleaned_listings
	GROUP BY host_scale
),

total_hosts AS (
	SELECT 
		COUNT(DISTINCT host_id) AS total_hosts
	FROM 'detailed_listings.csv'
),

total_listings AS (
	SELECT 
		COUNT(*) AS total_listings
	FROM 'detailed_listings.csv'
)

SELECT c.host_scale, c.hosts, c.listings,
	ROUND(c.hosts * 100.0 / h.total_hosts, 2) AS host_share,
	ROUND(c.listings * 100.0 / l.total_listings, 2) AS listing_share
FROM host_scale_count AS c
CROSS JOIN total_hosts AS h
CROSS JOIN total_listings AS l
ORDER BY c.hosts DESC;

,host_scale,hosts,listings,host_share,listing_share
0,Single-listing host,2784,2784,83.91,56.37
1,Small multi-listing host,436,1006,13.14,20.37
2,Medium operator,62,367,1.87,7.43
3,Large/professional operator,36,782,1.08,15.83


In [46]:
WITH calculated_host_listings_count_distribution AS (
	SELECT 
		calculated_host_listings_count,
		COUNT(DISTINCT host_id) AS number_of_hosts
	FROM 'detailed_listings.csv'
	GROUP BY calculated_host_listings_count
),

total_hosts AS (
	SELECT 
		COUNT(DISTINCT host_id) AS total
	FROM 'detailed_listings.csv'
)

SELECT 
	calculated_host_listings_count, 
	number_of_hosts, 
	ROUND(number_of_hosts/total * 100, 2) AS percent_of_all_hosts,
	ROUND(SUM(number_of_hosts) OVER (ORDER BY calculated_host_listings_count) * 100.0 / SUM(number_of_hosts) OVER (), 2) AS cumulative_percent
FROM calculated_host_listings_count_distribution AS c
CROSS JOIN total_hosts AS t
ORDER BY calculated_host_listings_count;

,calculated_host_listings_count,number_of_hosts,percent_of_all_hosts,cumulative_percent
0,1,2784,83.91,83.91
1,2,325,9.80,93.70
2,3,88,2.65,96.35
3,4,23,0.69,97.05
4,5,25,0.75,97.80
5,6,23,0.69,98.49
6,7,9,0.27,98.76
7,8,4,0.12,98.88
8,9,1,0.03,98.92
9,10,4,0.12,99.04


In [42]:
SELECT 
	MIN(calculated_host_listings_count) AS min_calculated_host_listings_count,
	MEDIAN(calculated_host_listings_count) AS median_calculated_host_listings_count,
	ROUND(AVG(calculated_host_listings_count), 2) AS avg_calculated_host_listings_count,
	MAX(calculated_host_listings_count) AS max_calculated_host_listings_count
FROM 'detailed_listings.csv';

,min_calculated_host_listings_count,median_calculated_host_listings_count,avg_calculated_host_listings_count,max_calculated_host_listings_count
0,1,1.0,6.06,69


In [27]:
WITH cleaned_listings AS (
	SELECT 
		id, last_scraped, source, name,
	
		host_id, host_name, host_location, host_is_superhost, host_listings_count, calculated_host_listings_count, host_identity_verified,
	
		neighbourhood_cleansed, latitude, longitude,
	
		property_type, room_type, accommodates, bedrooms, beds, amenities,
	
		bathrooms, bathrooms_text, 
		CASE 
			WHEN LOWER(bathrooms_text) LIKE '%private%' THEN 'Private'
			WHEN LOWER(bathrooms_text) LIKE '%shared%' THEN 'Shared'
			WHEN bathrooms_text IS NOT NULL THEN 'Standard'
			ELSE NULL
		END AS bathroom_type,
	
		price,
		TRY_CAST(
            REPLACE(
                REPLACE(price, '$', ''),
                ',', ''
            ) AS DECIMAL(10,2)
        ) AS cleaned_price,
	
		minimum_nights, maximum_nights, has_availability, availability_30, availability_60, availability_90, availability_365, availability_eoy, estimated_occupancy_l365d,  estimated_revenue_l365d,
	
		first_review, last_review, number_of_reviews, number_of_reviews_ltm, number_of_reviews_l30d, number_of_reviews_ly,
		CASE 
			WHEN number_of_reviews_l30d >= 1 THEN 'Recently Reviewed'
			WHEN number_of_reviews_ltm >= 1 THEN 'Reviewed in Last Year'
			WHEN number_of_reviews >= 1 THEN 'Historically Reviewed'
			WHEN number_of_reviews = 0 THEN 'Never Reviewed'
		END AS listing_activity_status,
	
		review_scores_rating, review_scores_accuracy, review_scores_communication, review_scores_location, review_scores_value, reviews_per_month
FROM 'detailed_listings.csv'
)

SELECT 
	bathroom_type,
	listing_activity_status,
	COUNT(*) AS listings
FROM cleaned_listings
GROUP BY bathroom_type, listing_activity_status
ORDER BY listings DESC;

,bathroom_type,listing_activity_status,listings
0,Standard,Recently Reviewed,1911
1,Standard,Reviewed in Last Year,1263
2,Standard,Historically Reviewed,614
3,Standard,Never Reviewed,539
4,Private,Recently Reviewed,152
5,Private,Reviewed in Last Year,88
6,Shared,Reviewed in Last Year,85
7,Shared,Recently Reviewed,70
8,Private,Historically Reviewed,57
9,Shared,Historically Reviewed,56


In [28]:
WITH cleaned_listings AS (
	SELECT 
		id, last_scraped, source, name,
	
		host_id, host_name, host_location, host_is_superhost, host_listings_count, calculated_host_listings_count, host_identity_verified,
	
		neighbourhood_cleansed, latitude, longitude,
	
		property_type, room_type, accommodates, bedrooms, beds, amenities,
	
		bathrooms, bathrooms_text, 
		CASE 
			WHEN LOWER(bathrooms_text) LIKE '%private%' THEN 'Private'
			WHEN LOWER(bathrooms_text) LIKE '%shared%' THEN 'Shared'
			WHEN bathrooms_text IS NOT NULL THEN 'Standard'
			ELSE NULL
		END AS bathroom_type,
	
		price,
		TRY_CAST(
            REPLACE(
                REPLACE(price, '$', ''),
                ',', ''
            ) AS DECIMAL(10,2)
        ) AS cleaned_price,
	
		minimum_nights, maximum_nights, has_availability, availability_30, availability_60, availability_90, availability_365, availability_eoy, estimated_occupancy_l365d,  estimated_revenue_l365d,
	
		first_review, last_review, number_of_reviews, number_of_reviews_ltm, number_of_reviews_l30d, number_of_reviews_ly,
		CASE 
			WHEN number_of_reviews_l30d >= 1 THEN 'Recently Reviewed'
			WHEN number_of_reviews_ltm >= 1 THEN 'Reviewed in Last Year'
			WHEN number_of_reviews >= 1 THEN 'Historically Reviewed'
			WHEN number_of_reviews = 0 THEN 'Never Reviewed'
		END AS listing_activity_status,
	
		review_scores_rating, review_scores_accuracy, review_scores_communication, review_scores_location, review_scores_value, reviews_per_month
FROM 'detailed_listings.csv'
)

SELECT 
	SUM(CASE WHEN bathroom_type IS NULL THEN 1 ELSE 0 END) AS null_bathroom_type,
	SUM(CASE WHEN listing_activity_status IS NULL THEN 1 ELSE 0 END) AS null_listing_activity_status
FROM cleaned_listings;

,null_bathroom_type,null_listing_activity_status
0,6.0,0.0


In [29]:
WITH cleaned_listings AS (
	SELECT 
		id, last_scraped, source, name,
	
		host_id, host_name, host_location, host_is_superhost, host_listings_count, calculated_host_listings_count, host_identity_verified,
	
		neighbourhood_cleansed, latitude, longitude,
	
		property_type, room_type, accommodates, bedrooms, beds, amenities,
	
		bathrooms, bathrooms_text, 
		CASE 
			WHEN LOWER(bathrooms_text) LIKE '%private%' THEN 'Private'
			WHEN LOWER(bathrooms_text) LIKE '%shared%' THEN 'Shared'
			WHEN bathrooms_text IS NOT NULL THEN 'Standard'
			ELSE NULL
		END AS bathroom_type,
	
		price,
		TRY_CAST(
            REPLACE(
                REPLACE(price, '$', ''),
                ',', ''
            ) AS DECIMAL(10,2)
        ) AS cleaned_price,
	
		minimum_nights, maximum_nights, has_availability, availability_30, availability_60, availability_90, availability_365, availability_eoy, estimated_occupancy_l365d,  estimated_revenue_l365d,
	
		first_review, last_review, number_of_reviews, number_of_reviews_ltm, number_of_reviews_l30d, number_of_reviews_ly,
		CASE 
			WHEN number_of_reviews_l30d >= 1 THEN 'Recently Reviewed'
			WHEN number_of_reviews_ltm >= 1 THEN 'Reviewed in Last Year'
			WHEN number_of_reviews >= 1 THEN 'Historically Reviewed'
			WHEN number_of_reviews = 0 THEN 'Never Reviewed'
		END AS listing_activity_status,
	
		review_scores_rating, review_scores_accuracy, review_scores_communication, review_scores_location, review_scores_value, reviews_per_month
FROM 'detailed_listings.csv'
)

SELECT 
	bathrooms,
	bathrooms_text,
	bathroom_type
FROM cleaned_listings
WHERE bathroom_type IS NULL;

,bathrooms,bathrooms_text,bathroom_type
0,17.0,None,None
1,NaN,None,None
2,NaN,None,None
3,2.0,None,None
4,2.0,None,None
5,2.0,None,None


In [75]:
WITH cleaned_listings AS (
	SELECT 
		id, last_scraped, source, name,
	
		host_id, host_name, host_location, host_is_superhost, host_listings_count, calculated_host_listings_count, host_identity_verified,
		CASE
			WHEN calculated_host_listings_count = 1 THEN 'Single-listing host'
			WHEN calculated_host_listings_count BETWEEN 2 AND 4 THEN 'Small multi-listing host'
			WHEN calculated_host_listings_count BETWEEN 5 AND 9 THEN 'Medium operator'
			WHEN calculated_host_listings_count >= 10 THEN 'Large/professional operator'
		END AS host_scale,
	
		neighbourhood_cleansed, latitude, longitude,
	
		property_type, room_type, accommodates, bedrooms, beds, amenities,
        LEN(
			FROM_JSON(amenities, '["VARCHAR"]')
    	) AS amenity_count,
	
		bathrooms, bathrooms_text, 
		CASE 
			WHEN LOWER(bathrooms_text) LIKE '%private%' THEN 'Private'
			WHEN LOWER(bathrooms_text) LIKE '%shared%' THEN 'Shared'
			WHEN bathrooms_text IS NOT NULL THEN 'Standard'
			ELSE NULL
		END AS bathroom_type,
	
		price,
		TRY_CAST(
            REPLACE(
                REPLACE(price, '$', ''),
                ',', ''
            ) AS DECIMAL(10,2)
        ) AS cleaned_price,
	
		minimum_nights, maximum_nights, has_availability, availability_30, availability_60, availability_90, availability_365, availability_eoy, estimated_occupancy_l365d,  estimated_revenue_l365d,
	
		first_review, last_review, number_of_reviews, number_of_reviews_ltm, number_of_reviews_l30d, number_of_reviews_ly,
		CASE 
			WHEN number_of_reviews_l30d >= 1 THEN 'Recently Reviewed'
			WHEN number_of_reviews_ltm >= 1 THEN 'Reviewed in Last Year'
			WHEN number_of_reviews >= 1 THEN 'Historically Reviewed'
			WHEN number_of_reviews = 0 THEN 'Never Reviewed'
		END AS listing_activity_status,
	
		review_scores_rating, review_scores_accuracy, review_scores_communication, review_scores_location, review_scores_value, reviews_per_month
FROM 'detailed_listings.csv'
)

SELECT
    SUM(CASE WHEN amenity_count = 0 THEN 1 ELSE 0 END) AS zero_amenity_count,
    MIN(amenity_count) AS min_amenity_count,
    MEDIAN(amenity_count) AS median_amenity_count,
    ROUND(AVG(amenity_count), 2) AS avg_amenity_count,
    MAX(amenity_count) AS max_amenity_count
FROM cleaned_listings;

,zero_amenity_count,min_amenity_count,median_amenity_count,avg_amenity_count,max_amenity_count
0,4.0,0,45.0,43.8,104


In [14]:
WITH cleaned_listings AS (
	
	SELECT 
		id, last_scraped, source, name,
	
		host_id, host_name, host_location, host_is_superhost, host_listings_count, calculated_host_listings_count, host_identity_verified,
		CASE
			WHEN calculated_host_listings_count = 1 THEN 'Single-listing host'
			WHEN calculated_host_listings_count BETWEEN 2 AND 4 THEN 'Small multi-listing host'
			WHEN calculated_host_listings_count BETWEEN 5 AND 9 THEN 'Medium operator'
			WHEN calculated_host_listings_count >= 10 THEN 'Large/professional operator'
		END AS host_scale,
	
		neighbourhood_cleansed, latitude, longitude,
	
		property_type, 
		CASE 
			WHEN property_type = 'Tiny home' THEN 'Specialty/Other'
			WHEN LOWER(property_type) LIKE '%home%' OR LOWER(property_type) LIKE '%bungalow%' OR LOWER(property_type) LIKE '%cottage%' THEN 'House/Home'
			WHEN LOWER(property_type) LIKE '%apartment%' OR LOWER(property_type) LIKE '%rental unit%' OR LOWER(property_type) LIKE '%loft%' THEN 'Apartment/Rental Unit'
			WHEN LOWER(property_type) LIKE '%condo%' THEN 'Condo'
			WHEN LOWER(property_type) LIKE '%townhouse%' THEN 'Townhouse'
			WHEN LOWER(property_type) LIKE '%guest%' THEN 'Guesthouse'
			WHEN LOWER(property_type) LIKE '%hotel%' OR LOWER(property_type) LIKE '%hostel%' OR LOWER(property_type) LIKE '%bed and breakfast%' THEN 'Hotel/Hospitality'
			WHEN LOWER(property_type) LIKE '%villa%' THEN 'Villa'
			ELSE 'Speciality/Other'
		END AS property_category,
	
		room_type, accommodates, bedrooms, beds, amenities,
		 LEN(
			FROM_JSON(amenities, '["VARCHAR"]')
    	) AS amenity_count,

		bathrooms, bathrooms_text, 
		CASE 
			WHEN LOWER(bathrooms_text) LIKE '%private%' THEN 'Private'
			WHEN LOWER(bathrooms_text) LIKE '%shared%' THEN 'Shared'
			WHEN bathrooms_text IS NOT NULL THEN 'Standard'
			ELSE NULL
		END AS bathroom_type,
	
		price,
		TRY_CAST(
            REPLACE(
                REPLACE(price, '$', ''),
                ',', ''
            ) AS DECIMAL(10,2)
        ) AS cleaned_price,
	
		minimum_nights, maximum_nights, has_availability, availability_30, availability_60, availability_90, availability_365, availability_eoy, estimated_occupancy_l365d,  estimated_revenue_l365d,
	
		first_review, last_review, number_of_reviews, number_of_reviews_ltm, number_of_reviews_l30d, number_of_reviews_ly,
		CASE 
			WHEN number_of_reviews_l30d >= 1 THEN 'Recently Reviewed'
			WHEN number_of_reviews_ltm >= 1 THEN 'Reviewed in Last Year'
			WHEN number_of_reviews >= 1 THEN 'Historically Reviewed'
			WHEN number_of_reviews = 0 THEN 'Never Reviewed'
		END AS listing_activity_status,
	
		review_scores_rating, review_scores_accuracy, review_scores_communication, review_scores_location, review_scores_value, reviews_per_month
FROM 'detailed_listings.csv'
	
)

SELECT
    property_type,
    COUNT(*) AS listings
FROM cleaned_listings
GROUP BY property_type
ORDER BY listings DESC;

,property_type,listings
0,Entire home,1589
1,Entire rental unit,1012
2,Entire condo,486
3,Private room in home,362
4,Entire guest suite,352
5,Entire townhouse,344
6,Entire guesthouse,294
7,Private room in townhouse,68
8,Room in hotel,65
9,Entire loft,60


In [15]:
WITH cleaned_listings AS (
	
	SELECT 
		id, last_scraped, source, name,
	
		host_id, host_name, host_location, host_is_superhost, host_listings_count, calculated_host_listings_count, host_identity_verified,
		CASE
			WHEN calculated_host_listings_count = 1 THEN 'Single-listing host'
			WHEN calculated_host_listings_count BETWEEN 2 AND 4 THEN 'Small multi-listing host'
			WHEN calculated_host_listings_count BETWEEN 5 AND 9 THEN 'Medium operator'
			WHEN calculated_host_listings_count >= 10 THEN 'Large/professional operator'
		END AS host_scale,
	
		neighbourhood_cleansed, latitude, longitude,
	
		property_type, 
		CASE 
			WHEN property_type = 'Tiny home' THEN 'Specialty/Other'
			WHEN LOWER(property_type) LIKE '%home%' OR LOWER(property_type) LIKE '%bungalow%' OR LOWER(property_type) LIKE '%cottage%' THEN 'House/Home'
			WHEN LOWER(property_type) LIKE '%apartment%' OR LOWER(property_type) LIKE '%rental unit%' OR LOWER(property_type) LIKE '%loft%' THEN 'Apartment/Rental Unit'
			WHEN LOWER(property_type) LIKE '%condo%' THEN 'Condo'
			WHEN LOWER(property_type) LIKE '%townhouse%' THEN 'Townhouse'
			WHEN LOWER(property_type) LIKE '%guest%' THEN 'Guesthouse'
			WHEN LOWER(property_type) LIKE '%hotel%' OR LOWER(property_type) LIKE '%hostel%' OR LOWER(property_type) LIKE '%bed and breakfast%' THEN 'Hotel/Hospitality'
			WHEN LOWER(property_type) LIKE '%villa%' THEN 'Villa'
			ELSE 'Speciality/Other'
		END AS property_category,
	
		room_type, accommodates, bedrooms, beds, amenities,
		 LEN(
			FROM_JSON(amenities, '["VARCHAR"]')
    	) AS amenity_count,

		bathrooms, bathrooms_text, 
		CASE 
			WHEN LOWER(bathrooms_text) LIKE '%private%' THEN 'Private'
			WHEN LOWER(bathrooms_text) LIKE '%shared%' THEN 'Shared'
			WHEN bathrooms_text IS NOT NULL THEN 'Standard'
			ELSE NULL
		END AS bathroom_type,
	
		price,
		TRY_CAST(
            REPLACE(
                REPLACE(price, '$', ''),
                ',', ''
            ) AS DECIMAL(10,2)
        ) AS cleaned_price,
	
		minimum_nights, maximum_nights, has_availability, availability_30, availability_60, availability_90, availability_365, availability_eoy, estimated_occupancy_l365d,  estimated_revenue_l365d,
	
		first_review, last_review, number_of_reviews, number_of_reviews_ltm, number_of_reviews_l30d, number_of_reviews_ly,
		CASE 
			WHEN number_of_reviews_l30d >= 1 THEN 'Recently Reviewed'
			WHEN number_of_reviews_ltm >= 1 THEN 'Reviewed in Last Year'
			WHEN number_of_reviews >= 1 THEN 'Historically Reviewed'
			WHEN number_of_reviews = 0 THEN 'Never Reviewed'
		END AS listing_activity_status,
	
		review_scores_rating, review_scores_accuracy, review_scores_communication, review_scores_location, review_scores_value, reviews_per_month
FROM 'detailed_listings.csv'
	
)

SELECT
    property_category,
    property_type,
    COUNT(*) AS listings
FROM cleaned_listings
GROUP BY property_category, property_type
ORDER BY property_category, listings DESC;

,property_category,property_type,listings
0,Apartment/Rental Unit,Entire rental unit,1012
1,Apartment/Rental Unit,Entire loft,60
2,Apartment/Rental Unit,Private room in rental unit,50
3,Apartment/Rental Unit,Entire serviced apartment,2
4,Apartment/Rental Unit,Private room in serviced apartment,1
5,Condo,Entire condo,486
6,Condo,Private room in condo,15
7,Guesthouse,Entire guest suite,352
8,Guesthouse,Entire guesthouse,294
9,Guesthouse,Private room in guest suite,18


In [17]:
WITH cleaned_listings AS (
	
	SELECT 
		id, last_scraped, source, name,
	
		host_id, host_name, host_location, host_is_superhost, host_listings_count, calculated_host_listings_count, host_identity_verified,
		CASE
			WHEN calculated_host_listings_count = 1 THEN 'Single-listing host'
			WHEN calculated_host_listings_count BETWEEN 2 AND 4 THEN 'Small multi-listing host'
			WHEN calculated_host_listings_count BETWEEN 5 AND 9 THEN 'Medium operator'
			WHEN calculated_host_listings_count >= 10 THEN 'Large/professional operator'
		END AS host_scale,
	
		neighbourhood_cleansed, latitude, longitude,
	
		property_type, 
		CASE 
			WHEN property_type = 'Tiny home' THEN 'Specialty/Other'
			WHEN LOWER(property_type) LIKE '%home%' OR LOWER(property_type) LIKE '%bungalow%' OR LOWER(property_type) LIKE '%cottage%' THEN 'House/Home'
			WHEN LOWER(property_type) LIKE '%apartment%' OR LOWER(property_type) LIKE '%rental unit%' OR LOWER(property_type) LIKE '%loft%' THEN 'Apartment/Rental Unit'
			WHEN LOWER(property_type) LIKE '%condo%' THEN 'Condo'
			WHEN LOWER(property_type) LIKE '%townhouse%' THEN 'Townhouse'
			WHEN LOWER(property_type) LIKE '%guest%' THEN 'Guesthouse'
			WHEN LOWER(property_type) LIKE '%hotel%' OR LOWER(property_type) LIKE '%hostel%' OR LOWER(property_type) LIKE '%bed and breakfast%' THEN 'Hotel/Hospitality'
			WHEN LOWER(property_type) LIKE '%villa%' THEN 'Villa'
			ELSE 'Speciality/Other'
		END AS property_category,
	
		room_type, accommodates, bedrooms, beds, amenities,
		 LEN(
			FROM_JSON(amenities, '["VARCHAR"]')
    	) AS amenity_count,

		bathrooms, bathrooms_text, 
		CASE 
			WHEN LOWER(bathrooms_text) LIKE '%private%' THEN 'Private'
			WHEN LOWER(bathrooms_text) LIKE '%shared%' THEN 'Shared'
			WHEN bathrooms_text IS NOT NULL THEN 'Standard'
			ELSE NULL
		END AS bathroom_type,
	
		price,
		TRY_CAST(
            REPLACE(
                REPLACE(price, '$', ''),
                ',', ''
            ) AS DECIMAL(10,2)
        ) AS cleaned_price,
	
		minimum_nights, maximum_nights, has_availability, availability_30, availability_60, availability_90, availability_365, availability_eoy, estimated_occupancy_l365d,  estimated_revenue_l365d,
	
		first_review, last_review, number_of_reviews, number_of_reviews_ltm, number_of_reviews_l30d, number_of_reviews_ly,
		CASE 
			WHEN number_of_reviews_l30d >= 1 THEN 'Recently Reviewed'
			WHEN number_of_reviews_ltm >= 1 THEN 'Reviewed in Last Year'
			WHEN number_of_reviews >= 1 THEN 'Historically Reviewed'
			WHEN number_of_reviews = 0 THEN 'Never Reviewed'
		END AS listing_activity_status,
	
		review_scores_rating, review_scores_accuracy, review_scores_communication, review_scores_location, review_scores_value, reviews_per_month
FROM 'detailed_listings.csv'
	
)

SELECT 
	SUM(CASE WHEN property_category IS NULL THEN 1 ELSE 0 END) AS null_property_category,
	COUNT(property_category) AS category_count
FROM cleaned_listings;

,null_property_category,category_count
0,0.0,4939


In [34]:
/* cleaned_listings creation and QA check */ 

WITH base_listings AS (
	SELECT 
		id, last_scraped, source, name,
	
		host_id, host_name, host_location, 
		CASE 
			WHEN host_location IS NULL THEN 'No Location'
			WHEN LOWER(host_location) LIKE '%denver%' THEN 'Denver'
			WHEN TRIM(LOWER(host_location)) LIKE '%, co' OR LOWER(host_location) LIKE '%colorado%' THEN 'Other Colorado'
			WHEN TRIM(LOWER(host_location)) LIKE '%, __' OR LOWER(host_location) LIKE '%united states%' THEN 'Other US State'
			ELSE 'Other Country'
		END AS host_location_category,
	
		host_is_superhost, host_listings_count, calculated_host_listings_count, host_identity_verified,
		CASE
			WHEN calculated_host_listings_count = 1 THEN 'Single-listing host'
			WHEN calculated_host_listings_count BETWEEN 2 AND 4 THEN 'Small multi-listing host'
			WHEN calculated_host_listings_count BETWEEN 5 AND 9 THEN 'Medium operator'
			WHEN calculated_host_listings_count >= 10 THEN 'Large/professional operator'
		END AS host_scale,
	
		neighbourhood_cleansed, latitude, longitude,
	
		property_type, 
		CASE 
			WHEN property_type = 'Tiny home' THEN 'Specialty/Other'
			WHEN LOWER(property_type) LIKE '%home%' OR LOWER(property_type) LIKE '%bungalow%' OR LOWER(property_type) LIKE '%cottage%' THEN 'House/Home'
			WHEN LOWER(property_type) LIKE '%apartment%' OR LOWER(property_type) LIKE '%rental unit%' OR LOWER(property_type) LIKE '%loft%' THEN 'Apartment/Rental Unit'
			WHEN LOWER(property_type) LIKE '%condo%' THEN 'Condo'
			WHEN LOWER(property_type) LIKE '%townhouse%' THEN 'Townhouse'
			WHEN LOWER(property_type) LIKE '%guest%' THEN 'Guesthouse'
			WHEN LOWER(property_type) LIKE '%hotel%' OR LOWER(property_type) LIKE '%hostel%' OR LOWER(property_type) LIKE '%bed and breakfast%' THEN 'Hotel/Hospitality'
			WHEN LOWER(property_type) LIKE '%villa%' THEN 'Villa'
			ELSE 'Speciality/Other'
		END AS property_category,
	
		room_type, accommodates, bedrooms, beds, amenities,
		 LEN(
			FROM_JSON(amenities, '["VARCHAR"]')
    	) AS amenity_count,

		bathrooms, bathrooms_text, 
		CASE 
			WHEN LOWER(bathrooms_text) LIKE '%private%' THEN 'Private'
			WHEN LOWER(bathrooms_text) LIKE '%shared%' THEN 'Shared'
			WHEN bathrooms_text IS NOT NULL THEN 'Standard'
			ELSE NULL
		END AS bathroom_type,
	
		price,
		TRY_CAST(
            REPLACE(
                REPLACE(price, '$', ''),
                ',', ''
            ) AS DECIMAL(10,2)
        ) AS cleaned_price,
	
		minimum_nights, maximum_nights, has_availability, availability_30, availability_60, availability_90, availability_365, availability_eoy, estimated_occupancy_l365d,  estimated_revenue_l365d,
		CASE 
			WHEN minimum_nights <= 6 THEN 'Short stay'
			WHEN minimum_nights <= 27 THEN 'Medium Stay'
			WHEN minimum_nights <= 45 THEN 'Monthly stay'
			WHEN minimum_nights >= 46 THEN 'Extended stay'
		ELSE NULL
		END AS stay_policy,
	
		first_review, last_review, number_of_reviews, number_of_reviews_ltm, number_of_reviews_l30d, number_of_reviews_ly,
		CASE 
			WHEN number_of_reviews_l30d >= 1 THEN 'Recently Reviewed'
			WHEN number_of_reviews_ltm >= 1 THEN 'Reviewed in Last Year'
			WHEN number_of_reviews >= 1 THEN 'Historically Reviewed'
			WHEN number_of_reviews = 0 THEN 'Never Reviewed'
		END AS listing_activity_status,
	
		review_scores_rating, review_scores_accuracy, review_scores_communication, review_scores_location, review_scores_value, reviews_per_month
FROM 'detailed_listings.csv'
),

room_type_price_quartiles AS (
	SELECT 
		room_type,
		QUANTILE_CONT(cleaned_price, 0.25) AS q1,
		QUANTILE_CONT(cleaned_price, 0.75) AS q3,
		QUANTILE_CONT(cleaned_price, 0.75) - QUANTILE_CONT(cleaned_price, 0.25) AS iqr
	FROM base_listings
	WHERE cleaned_price IS NOT NULL
	GROUP BY room_type
),

room_type_price_stats AS (
	SELECT 
		room_type,
		q1,
		q3,
		iqr,
		q1 - (1.5 * iqr) AS lower_bound,
		q3 + (1.5 * iqr) AS upper_bound
	FROM room_type_price_quartiles
),

cleaned_listings AS (
	SELECT 
		b.*,
		CASE 
			WHEN b.cleaned_price IS NULL THEN 'Missing price'
			WHEN b.cleaned_price < p.lower_bound THEN 'Low price outlier'
			WHEN b.cleaned_price > p.upper_bound THEN 'High price outlier'
			ELSE 'Typical range'
		END AS price_status
	FROM base_listings AS b
	LEFT JOIN room_type_price_stats AS p
		ON b.room_type = p.room_type
),

duplicate_ids AS (
	SELECT 
		id,
		COUNT(*) AS occurrences
	FROM cleaned_listings
	GROUP BY id
	HAVING COUNT(*) > 1
)

SELECT 
	COUNT(*) AS total_rows,
	COUNT(DISTINCT id) AS distinct_listing_ids,
	SUM(CASE WHEN id IS NULL THEN 1 ELSE 0 END) AS null_listing_ids,
	(SELECT COUNT(*) FROM duplicate_ids) AS duplicate_listing_ids, 
	SUM(CASE WHEN price IS NOT NULL AND cleaned_price IS NULL THEN 1 ELSE 0 END) AS failed_price_conversions,
	SUM(CASE WHEN host_scale IS NULL THEN 1 ELSE 0 END) AS null_host_scale_values,
	SUM(CASE WHEN listing_activity_status IS NULL THEN 1 ELSE 0 END) AS null_listing_activity_status,
	SUM(CASE WHEN amenity_count < 0 THEN 1 ELSE 0 END) AS impossible_amenity_count_values,
	SUM(CASE WHEN property_category IS NULL THEN 1 ELSE 0 END) AS null_property_category,
	SUM(CASE WHEN stay_policy IS NULL AND minimum_nights IS NOT NULL THEN 1 ELSE 0 END) AS incorrect_null_stay_policy,
	SUM(CASE WHEN price_status IS NULL THEN 1 ELSE 0 END) AS null_price_status,
	SUM(CASE WHEN host_location_category IS NULL THEN 1 ELSE 0 END) AS null_host_location_category
FROM cleaned_listings;

,total_rows,distinct_listing_ids,null_listing_ids,duplicate_listing_ids,failed_price_conversions,null_host_scale_values,null_listing_activity_status,impossible_amenity_count_values,null_property_category,incorrect_null_stay_policy,null_price_status,null_host_location_category
0,4939,4939,0.0,0,0.0,0.0,0.0,0.0,0.0,0.0,0.0,0.0


In [19]:
WITH cleaned_listings AS (
	
	SELECT 
		id, last_scraped, source, name,
	
		host_id, host_name, host_location, host_is_superhost, host_listings_count, calculated_host_listings_count, host_identity_verified,
		CASE
			WHEN calculated_host_listings_count = 1 THEN 'Single-listing host'
			WHEN calculated_host_listings_count BETWEEN 2 AND 4 THEN 'Small multi-listing host'
			WHEN calculated_host_listings_count BETWEEN 5 AND 9 THEN 'Medium operator'
			WHEN calculated_host_listings_count >= 10 THEN 'Large/professional operator'
		END AS host_scale,
	
		neighbourhood_cleansed, latitude, longitude,
	
		property_type, 
		CASE 
			WHEN property_type = 'Tiny home' THEN 'Specialty/Other'
			WHEN LOWER(property_type) LIKE '%home%' OR LOWER(property_type) LIKE '%bungalow%' OR LOWER(property_type) LIKE '%cottage%' THEN 'House/Home'
			WHEN LOWER(property_type) LIKE '%apartment%' OR LOWER(property_type) LIKE '%rental unit%' OR LOWER(property_type) LIKE '%loft%' THEN 'Apartment/Rental Unit'
			WHEN LOWER(property_type) LIKE '%condo%' THEN 'Condo'
			WHEN LOWER(property_type) LIKE '%townhouse%' THEN 'Townhouse'
			WHEN LOWER(property_type) LIKE '%guest%' THEN 'Guesthouse'
			WHEN LOWER(property_type) LIKE '%hotel%' OR LOWER(property_type) LIKE '%hostel%' OR LOWER(property_type) LIKE '%bed and breakfast%' THEN 'Hotel/Hospitality'
			WHEN LOWER(property_type) LIKE '%villa%' THEN 'Villa'
			ELSE 'Speciality/Other'
		END AS property_category,
	
		room_type, accommodates, bedrooms, beds, amenities,
		 LEN(
			FROM_JSON(amenities, '["VARCHAR"]')
    	) AS amenity_count,

		bathrooms, bathrooms_text, 
		CASE 
			WHEN LOWER(bathrooms_text) LIKE '%private%' THEN 'Private'
			WHEN LOWER(bathrooms_text) LIKE '%shared%' THEN 'Shared'
			WHEN bathrooms_text IS NOT NULL THEN 'Standard'
			ELSE NULL
		END AS bathroom_type,
	
		price,
		TRY_CAST(
            REPLACE(
                REPLACE(price, '$', ''),
                ',', ''
            ) AS DECIMAL(10,2)
        ) AS cleaned_price,
	
		minimum_nights, maximum_nights, has_availability, availability_30, availability_60, availability_90, availability_365, availability_eoy, estimated_occupancy_l365d,  estimated_revenue_l365d,
		CASE 
			WHEN minimum_nights <= 6 THEN 'Short stay'
			WHEN minimum_nights <= 27 THEN 'Medium Stay'
			WHEN minimum_nights <= 45 THEN 'Monthly stay'
			WHEN minimum_nights >= 46 THEN 'Extended stay'
		ELSE NULL
		END AS stay_policy,
	
		first_review, last_review, number_of_reviews, number_of_reviews_ltm, number_of_reviews_l30d, number_of_reviews_ly,
		CASE 
			WHEN number_of_reviews_l30d >= 1 THEN 'Recently Reviewed'
			WHEN number_of_reviews_ltm >= 1 THEN 'Reviewed in Last Year'
			WHEN number_of_reviews >= 1 THEN 'Historically Reviewed'
			WHEN number_of_reviews = 0 THEN 'Never Reviewed'
		END AS listing_activity_status,
	
		review_scores_rating, review_scores_accuracy, review_scores_communication, review_scores_location, review_scores_value, reviews_per_month
FROM 'detailed_listings.csv'
	
)

SELECT
    stay_policy,
    COUNT(*) AS listings,
    ROUND(COUNT(*) * 100.0 / SUM(COUNT(*)) OVER (), 2) AS pct_of_listings
FROM cleaned_listings
GROUP BY stay_policy
ORDER BY listings DESC;

,stay_policy,listings,pct_of_listings
0,Short stay,2457,49.75
1,Monthly stay,2352,47.62
2,Extended stay,96,1.94
3,Medium Stay,33,0.67
4,None,1,0.02


In [20]:
WITH cleaned_listings AS (
	
	SELECT 
		id, last_scraped, source, name,
	
		host_id, host_name, host_location, host_is_superhost, host_listings_count, calculated_host_listings_count, host_identity_verified,
		CASE
			WHEN calculated_host_listings_count = 1 THEN 'Single-listing host'
			WHEN calculated_host_listings_count BETWEEN 2 AND 4 THEN 'Small multi-listing host'
			WHEN calculated_host_listings_count BETWEEN 5 AND 9 THEN 'Medium operator'
			WHEN calculated_host_listings_count >= 10 THEN 'Large/professional operator'
		END AS host_scale,
	
		neighbourhood_cleansed, latitude, longitude,
	
		property_type, 
		CASE 
			WHEN property_type = 'Tiny home' THEN 'Specialty/Other'
			WHEN LOWER(property_type) LIKE '%home%' OR LOWER(property_type) LIKE '%bungalow%' OR LOWER(property_type) LIKE '%cottage%' THEN 'House/Home'
			WHEN LOWER(property_type) LIKE '%apartment%' OR LOWER(property_type) LIKE '%rental unit%' OR LOWER(property_type) LIKE '%loft%' THEN 'Apartment/Rental Unit'
			WHEN LOWER(property_type) LIKE '%condo%' THEN 'Condo'
			WHEN LOWER(property_type) LIKE '%townhouse%' THEN 'Townhouse'
			WHEN LOWER(property_type) LIKE '%guest%' THEN 'Guesthouse'
			WHEN LOWER(property_type) LIKE '%hotel%' OR LOWER(property_type) LIKE '%hostel%' OR LOWER(property_type) LIKE '%bed and breakfast%' THEN 'Hotel/Hospitality'
			WHEN LOWER(property_type) LIKE '%villa%' THEN 'Villa'
			ELSE 'Speciality/Other'
		END AS property_category,
	
		room_type, accommodates, bedrooms, beds, amenities,
		 LEN(
			FROM_JSON(amenities, '["VARCHAR"]')
    	) AS amenity_count,

		bathrooms, bathrooms_text, 
		CASE 
			WHEN LOWER(bathrooms_text) LIKE '%private%' THEN 'Private'
			WHEN LOWER(bathrooms_text) LIKE '%shared%' THEN 'Shared'
			WHEN bathrooms_text IS NOT NULL THEN 'Standard'
			ELSE NULL
		END AS bathroom_type,
	
		price,
		TRY_CAST(
            REPLACE(
                REPLACE(price, '$', ''),
                ',', ''
            ) AS DECIMAL(10,2)
        ) AS cleaned_price,
	
		minimum_nights, maximum_nights, has_availability, availability_30, availability_60, availability_90, availability_365, availability_eoy, estimated_occupancy_l365d,  estimated_revenue_l365d,
		CASE 
			WHEN minimum_nights <= 6 THEN 'Short stay'
			WHEN minimum_nights <= 27 THEN 'Medium Stay'
			WHEN minimum_nights <= 45 THEN 'Monthly stay'
			WHEN minimum_nights >= 46 THEN 'Extended stay'
		ELSE NULL
		END AS stay_policy,
	
		first_review, last_review, number_of_reviews, number_of_reviews_ltm, number_of_reviews_l30d, number_of_reviews_ly,
		CASE 
			WHEN number_of_reviews_l30d >= 1 THEN 'Recently Reviewed'
			WHEN number_of_reviews_ltm >= 1 THEN 'Reviewed in Last Year'
			WHEN number_of_reviews >= 1 THEN 'Historically Reviewed'
			WHEN number_of_reviews = 0 THEN 'Never Reviewed'
		END AS listing_activity_status,
	
		review_scores_rating, review_scores_accuracy, review_scores_communication, review_scores_location, review_scores_value, reviews_per_month
FROM 'detailed_listings.csv'
	
)

SELECT
    stay_policy,
    MIN(minimum_nights) AS min_nights,
    MAX(minimum_nights) AS max_nights,
    COUNT(*) AS listings
FROM cleaned_listings
GROUP BY stay_policy
ORDER BY min_nights;

,stay_policy,min_nights,max_nights,listings
0,Short stay,1,6,2457
1,Medium Stay,7,21,33
2,Monthly stay,28,45,2352
3,Extended stay,56,500,96
4,None,<NA>,<NA>,1


## detailed_calendar.csv analysis-ready table

In [31]:
/* cleaned_calendar creation and QA check */

WITH base_listings AS (
	SELECT 
		id, last_scraped, source, name,
	
		host_id, host_name, host_location, 
		CASE 
			WHEN host_location IS NULL THEN 'No Location'
			WHEN LOWER(host_location) LIKE '%denver%' THEN 'Denver'
			WHEN TRIM(LOWER(host_location)) LIKE '%, co' OR LOWER(host_location) LIKE '%colorado%' THEN 'Other Colorado'
			WHEN TRIM(LOWER(host_location)) LIKE '%, __' OR LOWER(host_location) LIKE '%united states%' THEN 'Other US State'
			ELSE 'Other Country'
		END AS host_location_category,
	
		host_is_superhost, host_listings_count, calculated_host_listings_count, host_identity_verified,
		CASE
			WHEN calculated_host_listings_count = 1 THEN 'Single-listing host'
			WHEN calculated_host_listings_count BETWEEN 2 AND 4 THEN 'Small multi-listing host'
			WHEN calculated_host_listings_count BETWEEN 5 AND 9 THEN 'Medium operator'
			WHEN calculated_host_listings_count >= 10 THEN 'Large/professional operator'
		END AS host_scale,
	
		neighbourhood_cleansed, latitude, longitude,
	
		property_type, 
		CASE 
			WHEN property_type = 'Tiny home' THEN 'Specialty/Other'
			WHEN LOWER(property_type) LIKE '%home%' OR LOWER(property_type) LIKE '%bungalow%' OR LOWER(property_type) LIKE '%cottage%' THEN 'House/Home'
			WHEN LOWER(property_type) LIKE '%apartment%' OR LOWER(property_type) LIKE '%rental unit%' OR LOWER(property_type) LIKE '%loft%' THEN 'Apartment/Rental Unit'
			WHEN LOWER(property_type) LIKE '%condo%' THEN 'Condo'
			WHEN LOWER(property_type) LIKE '%townhouse%' THEN 'Townhouse'
			WHEN LOWER(property_type) LIKE '%guest%' THEN 'Guesthouse'
			WHEN LOWER(property_type) LIKE '%hotel%' OR LOWER(property_type) LIKE '%hostel%' OR LOWER(property_type) LIKE '%bed and breakfast%' THEN 'Hotel/Hospitality'
			WHEN LOWER(property_type) LIKE '%villa%' THEN 'Villa'
			ELSE 'Speciality/Other'
		END AS property_category,
	
		room_type, accommodates, bedrooms, beds, amenities,
		 LEN(
			FROM_JSON(amenities, '["VARCHAR"]')
    	) AS amenity_count,

		bathrooms, bathrooms_text, 
		CASE 
			WHEN LOWER(bathrooms_text) LIKE '%private%' THEN 'Private'
			WHEN LOWER(bathrooms_text) LIKE '%shared%' THEN 'Shared'
			WHEN bathrooms_text IS NOT NULL THEN 'Standard'
			ELSE NULL
		END AS bathroom_type,
	
		price,
		TRY_CAST(
            REPLACE(
                REPLACE(price, '$', ''),
                ',', ''
            ) AS DECIMAL(10,2)
        ) AS cleaned_price,
	
		minimum_nights, maximum_nights, has_availability, availability_30, availability_60, availability_90, availability_365, availability_eoy, estimated_occupancy_l365d,  estimated_revenue_l365d,
		CASE 
			WHEN minimum_nights <= 6 THEN 'Short stay'
			WHEN minimum_nights <= 27 THEN 'Medium Stay'
			WHEN minimum_nights <= 45 THEN 'Monthly stay'
			WHEN minimum_nights >= 46 THEN 'Extended stay'
		ELSE NULL
		END AS stay_policy,
	
		first_review, last_review, number_of_reviews, number_of_reviews_ltm, number_of_reviews_l30d, number_of_reviews_ly,
		CASE 
			WHEN number_of_reviews_l30d >= 1 THEN 'Recently Reviewed'
			WHEN number_of_reviews_ltm >= 1 THEN 'Reviewed in Last Year'
			WHEN number_of_reviews >= 1 THEN 'Historically Reviewed'
			WHEN number_of_reviews = 0 THEN 'Never Reviewed'
		END AS listing_activity_status,
	
		review_scores_rating, review_scores_accuracy, review_scores_communication, review_scores_location, review_scores_value, reviews_per_month
FROM 'detailed_listings.csv'
),

room_type_price_quartiles AS (
	SELECT 
		room_type,
		QUANTILE_CONT(cleaned_price, 0.25) AS q1,
		QUANTILE_CONT(cleaned_price, 0.75) AS q3,
		QUANTILE_CONT(cleaned_price, 0.75) - QUANTILE_CONT(cleaned_price, 0.25) AS iqr
	FROM base_listings
	WHERE cleaned_price IS NOT NULL
	GROUP BY room_type
),

room_type_price_stats AS (
	SELECT 
		room_type,
		q1,
		q3,
		iqr,
		q1 - (1.5 * iqr) AS lower_bound,
		q3 + (1.5 * iqr) AS upper_bound
	FROM room_type_price_quartiles
),

cleaned_listings AS (
	SELECT 
		b.*,
		CASE 
			WHEN b.cleaned_price IS NULL THEN 'Missing price'
			WHEN b.cleaned_price < p.lower_bound THEN 'Low price outlier'
			WHEN b.cleaned_price > p.upper_bound THEN 'High price outlier'
			ELSE 'Typical range'
		END AS price_status
	FROM base_listings AS b
	LEFT JOIN room_type_price_stats AS p
		ON b.room_type = p.room_type
),

cleaned_calendar AS (
	SELECT 
		c.listing_id,	
		CAST(c.date AS DATE) AS date,
		c.available,
		c.minimum_nights,
		c.maximum_nights,
		YEAR(c.date) AS year,
		MONTH(c.date) AS month,
		CAST(DATE_TRUNC('month', c.date) AS DATE) AS year_month
	FROM 'detailed_calendar.csv' AS c
	INNER JOIN cleaned_listings AS l
		ON c.listing_id = l.id
),

duplicate_listing_dates AS (
	SELECT 
		listing_id
		date,
		COUNT(*) AS occurrences
	FROM cleaned_calendar
	GROUP BY listing_id, date
	HAVING COUNT(*) > 1
)

SELECT
	COUNT(*) AS total_rows,
	COUNT(DISTINCT listing_id) AS distinct_listing_ids,
	SUM(CASE WHEN listing_id IS NULL THEN 1 ELSE 0 END) AS null_listing_ids,
	SUM(CASE WHEN date IS NULL THEN 1 ELSE 0 END) AS null_dates,
	(SELECT COUNT(*) FROM duplicate_listing_dates) AS duplicate_listing_dates,
	MIN(date) AS min_date,
	MAX(date) AS max_date
FROM cleaned_calendar;

,total_rows,distinct_listing_ids,null_listing_ids,null_dates,duplicate_listing_dates,min_date,max_date
0,1802735,4939,0.0,0.0,0,2026-06-30 00:00:00+00:00,2027-07-01 00:00:00+00:00


## detailed_reviews.csv analysis-ready table

In [50]:
/* cleaned_reviews creation and QA check */ 

WITH base_listings AS (
	SELECT 
		id, last_scraped, source, name,
	
		host_id, host_name, host_location, 
		CASE 
			WHEN host_location IS NULL THEN 'No Location'
			WHEN LOWER(host_location) LIKE '%denver%' THEN 'Denver'
			WHEN TRIM(LOWER(host_location)) LIKE '%, co' OR LOWER(host_location) LIKE '%colorado%' THEN 'Other Colorado'
			WHEN TRIM(LOWER(host_location)) LIKE '%, __' OR LOWER(host_location) LIKE '%united states%' THEN 'Other US State'
			ELSE 'Other Country'
		END AS host_location_category,
	
		host_is_superhost, host_listings_count, calculated_host_listings_count, host_identity_verified,
		CASE
			WHEN calculated_host_listings_count = 1 THEN 'Single-listing host'
			WHEN calculated_host_listings_count BETWEEN 2 AND 4 THEN 'Small multi-listing host'
			WHEN calculated_host_listings_count BETWEEN 5 AND 9 THEN 'Medium operator'
			WHEN calculated_host_listings_count >= 10 THEN 'Large/professional operator'
		END AS host_scale,
	
		neighbourhood_cleansed, latitude, longitude,
	
		property_type, 
		CASE 
			WHEN property_type = 'Tiny home' THEN 'Specialty/Other'
			WHEN LOWER(property_type) LIKE '%home%' OR LOWER(property_type) LIKE '%bungalow%' OR LOWER(property_type) LIKE '%cottage%' THEN 'House/Home'
			WHEN LOWER(property_type) LIKE '%apartment%' OR LOWER(property_type) LIKE '%rental unit%' OR LOWER(property_type) LIKE '%loft%' THEN 'Apartment/Rental Unit'
			WHEN LOWER(property_type) LIKE '%condo%' THEN 'Condo'
			WHEN LOWER(property_type) LIKE '%townhouse%' THEN 'Townhouse'
			WHEN LOWER(property_type) LIKE '%guest%' THEN 'Guesthouse'
			WHEN LOWER(property_type) LIKE '%hotel%' OR LOWER(property_type) LIKE '%hostel%' OR LOWER(property_type) LIKE '%bed and breakfast%' THEN 'Hotel/Hospitality'
			WHEN LOWER(property_type) LIKE '%villa%' THEN 'Villa'
			ELSE 'Speciality/Other'
		END AS property_category,
	
		room_type, accommodates, bedrooms, beds, amenities,
		 LEN(
			FROM_JSON(amenities, '["VARCHAR"]')
    	) AS amenity_count,

		bathrooms, bathrooms_text, 
		CASE 
			WHEN LOWER(bathrooms_text) LIKE '%private%' THEN 'Private'
			WHEN LOWER(bathrooms_text) LIKE '%shared%' THEN 'Shared'
			WHEN bathrooms_text IS NOT NULL THEN 'Standard'
			ELSE NULL
		END AS bathroom_type,
	
		price,
		TRY_CAST(
            REPLACE(
                REPLACE(price, '$', ''),
                ',', ''
            ) AS DECIMAL(10,2)
        ) AS cleaned_price,
	
		minimum_nights, maximum_nights, has_availability, availability_30, availability_60, availability_90, availability_365, availability_eoy, estimated_occupancy_l365d,  estimated_revenue_l365d,
		CASE 
			WHEN minimum_nights <= 6 THEN 'Short stay'
			WHEN minimum_nights <= 27 THEN 'Medium Stay'
			WHEN minimum_nights <= 45 THEN 'Monthly stay'
			WHEN minimum_nights >= 46 THEN 'Extended stay'
		ELSE NULL
		END AS stay_policy,
	
		first_review, last_review, number_of_reviews, number_of_reviews_ltm, number_of_reviews_l30d, number_of_reviews_ly,
		CASE 
			WHEN number_of_reviews_l30d >= 1 THEN 'Recently Reviewed'
			WHEN number_of_reviews_ltm >= 1 THEN 'Reviewed in Last Year'
			WHEN number_of_reviews >= 1 THEN 'Historically Reviewed'
			WHEN number_of_reviews = 0 THEN 'Never Reviewed'
		END AS listing_activity_status,
	
		review_scores_rating, review_scores_accuracy, review_scores_communication, review_scores_location, review_scores_value, reviews_per_month
FROM 'detailed_listings.csv'
),

room_type_price_quartiles AS (
	SELECT 
		room_type,
		QUANTILE_CONT(cleaned_price, 0.25) AS q1,
		QUANTILE_CONT(cleaned_price, 0.75) AS q3,
		QUANTILE_CONT(cleaned_price, 0.75) - QUANTILE_CONT(cleaned_price, 0.25) AS iqr
	FROM base_listings
	WHERE cleaned_price IS NOT NULL
	GROUP BY room_type
),

room_type_price_stats AS (
	SELECT 
		room_type,
		q1,
		q3,
		iqr,
		q1 - (1.5 * iqr) AS lower_bound,
		q3 + (1.5 * iqr) AS upper_bound
	FROM room_type_price_quartiles
),

cleaned_listings AS (
	SELECT 
		b.*,
		CASE 
			WHEN b.cleaned_price IS NULL THEN 'Missing price'
			WHEN b.cleaned_price < p.lower_bound THEN 'Low price outlier'
			WHEN b.cleaned_price > p.upper_bound THEN 'High price outlier'
			ELSE 'Typical range'
		END AS price_status
	FROM base_listings AS b
	LEFT JOIN room_type_price_stats AS p
		ON b.room_type = p.room_type
),
	
cleaned_calendar AS (
	SELECT 
		c.listing_id,	
		CAST(c.date AS DATE) AS date,
		c.available,
		c.minimum_nights,
		c.maximum_nights,
		YEAR(c.date) AS year,
		MONTH(c.date) AS month,
		CAST(DATE_TRUNC('month', c.date) AS DATE) AS year_month
	FROM 'detailed_calendar.csv' AS c
	INNER JOIN cleaned_listings AS l
		ON c.listing_id = l.id
),

cleaned_reviews AS (
	SELECT 
		r.listing_id,
		r.id AS review_id,
		CAST(r.date AS DATE) AS date,
		r.reviewer_id,
		r.reviewer_name,
		r.comments,
		YEAR(r.date) AS year,
		MONTH(r.date) AS month,
		CAST(DATE_TRUNC('month', r.date) AS DATE) AS year_month
	FROM 'detailed_reviews.csv' AS r
	INNER JOIN cleaned_listings AS l
		ON r.listing_id = l.id
),

duplicate_review_ids AS (
	SELECT 
		review_id,
		COUNT(*) AS occurrences
	FROM cleaned_reviews
	GROUP BY review_id
	HAVING COUNT(*) > 1
)

SELECT 
	COUNT(*) AS total_rows,
	COUNT(DISTINCT listing_id) AS distinct_listing_ids,
	(SELECT COUNT(*) FROM duplicate_review_ids) AS duplicate_review_ids,
	SUM(CASE WHEN review_id IS NULL THEN 1 ELSE 0 END) AS null_review_ids,
	SUM(CASE WHEN listing_id IS NULL THEN 1 ELSE 0 END) AS null_listing_ids,
	SUM(CASE WHEN reviewer_id IS NULL THEN 1 ELSE 0 END) AS null_reviewer_ids,
	SUM(CASE WHEN reviewer_name IS NULL THEN 1 ELSE 0 END) AS null_reviewer_names,
	SUM(CASE WHEN date IS NULL THEN 1 ELSE 0 END) AS null_dates,
	MIN(date) AS min_date,
	MAX(date) AS max_date
FROM cleaned_reviews;

,total_rows,distinct_listing_ids,duplicate_review_ids,null_review_ids,null_listing_ids,null_reviewer_ids,null_reviewer_names,null_dates,min_date,max_date
0,354646,4301,0,0.0,0.0,0.0,0.0,0.0,2008-08-28 00:00:00+00:00,2026-06-30 00:00:00+00:00


In [36]:
SELECT 
	reviewer_name,
	COUNT(*) AS name_count
FROM 'detailed_reviews.csv'
GROUP BY reviewer_name
ORDER BY name_count DESC;

,reviewer_name,name_count
0,Michael,3466
1,Sarah,2891
2,David,2748
3,John,2470
4,Jennifer,2272
...,...,...
36353,Sunghak,1
36354,Cindy Lan,1
36355,Cav,1
36356,Cristofer,1


In [37]:
SELECT 
	COUNT(*) AS total_rows,
	COUNT(DISTINCT reviewer_name) AS names,
	COUNT(DISTINCT reviewer_id) AS reviewers
FROM 'detailed_reviews.csv';

,total_rows,names,reviewers
0,354741,36358,316556


In [38]:
SELECT 
	reviewer_name,
	reviewer_id,
	COUNT(*) AS occurrences
FROM 'detailed_reviews.csv'
GROUP BY reviewer_name, reviewer_id
ORDER BY occurrences DESC;

,reviewer_name,reviewer_id,occurrences
0,Travis,261185337,92
1,Angela,73366630,69
2,Laszlo,419669366,31
3,Andrew,906007,29
4,Kristen,247494246,27
...,...,...,...
316551,Kathy,86495184,1
316552,Rachel,206507211,1
316553,Grecia,523892353,1
316554,Tyler,175336620,1


## neighbourhoods.csv

In [53]:
SELECT * 
FROM 'neighbourhoods.csv';

,neighbourhood_group,neighbourhood
0,None,Athmar Park
1,None,Auraria
2,None,Baker
3,None,Barnum
4,None,Barnum West
...,...,...
73,None,West Colfax
74,None,West Highland
75,None,Westwood
76,None,Whittier


In [57]:
/* neighbourhoods.csv test to determine if cleaned CTE is needed and QA check */ 

WITH base_listings AS (
	SELECT 
		id, last_scraped, source, name,
	
		host_id, host_name, host_location, 
		CASE 
			WHEN host_location IS NULL THEN 'No Location'
			WHEN LOWER(host_location) LIKE '%denver%' THEN 'Denver'
			WHEN TRIM(LOWER(host_location)) LIKE '%, co' OR LOWER(host_location) LIKE '%colorado%' THEN 'Other Colorado'
			WHEN TRIM(LOWER(host_location)) LIKE '%, __' OR LOWER(host_location) LIKE '%united states%' THEN 'Other US State'
			ELSE 'Other Country'
		END AS host_location_category,
	
		host_is_superhost, host_listings_count, calculated_host_listings_count, host_identity_verified,
		CASE
			WHEN calculated_host_listings_count = 1 THEN 'Single-listing host'
			WHEN calculated_host_listings_count BETWEEN 2 AND 4 THEN 'Small multi-listing host'
			WHEN calculated_host_listings_count BETWEEN 5 AND 9 THEN 'Medium operator'
			WHEN calculated_host_listings_count >= 10 THEN 'Large/professional operator'
		END AS host_scale,
	
		neighbourhood_cleansed, latitude, longitude,
	
		property_type, 
		CASE 
			WHEN property_type = 'Tiny home' THEN 'Specialty/Other'
			WHEN LOWER(property_type) LIKE '%home%' OR LOWER(property_type) LIKE '%bungalow%' OR LOWER(property_type) LIKE '%cottage%' THEN 'House/Home'
			WHEN LOWER(property_type) LIKE '%apartment%' OR LOWER(property_type) LIKE '%rental unit%' OR LOWER(property_type) LIKE '%loft%' THEN 'Apartment/Rental Unit'
			WHEN LOWER(property_type) LIKE '%condo%' THEN 'Condo'
			WHEN LOWER(property_type) LIKE '%townhouse%' THEN 'Townhouse'
			WHEN LOWER(property_type) LIKE '%guest%' THEN 'Guesthouse'
			WHEN LOWER(property_type) LIKE '%hotel%' OR LOWER(property_type) LIKE '%hostel%' OR LOWER(property_type) LIKE '%bed and breakfast%' THEN 'Hotel/Hospitality'
			WHEN LOWER(property_type) LIKE '%villa%' THEN 'Villa'
			ELSE 'Speciality/Other'
		END AS property_category,
	
		room_type, accommodates, bedrooms, beds, amenities,
		 LEN(
			FROM_JSON(amenities, '["VARCHAR"]')
    	) AS amenity_count,

		bathrooms, bathrooms_text, 
		CASE 
			WHEN LOWER(bathrooms_text) LIKE '%private%' THEN 'Private'
			WHEN LOWER(bathrooms_text) LIKE '%shared%' THEN 'Shared'
			WHEN bathrooms_text IS NOT NULL THEN 'Standard'
			ELSE NULL
		END AS bathroom_type,
	
		price,
		TRY_CAST(
            REPLACE(
                REPLACE(price, '$', ''),
                ',', ''
            ) AS DECIMAL(10,2)
        ) AS cleaned_price,
	
		minimum_nights, maximum_nights, has_availability, availability_30, availability_60, availability_90, availability_365, availability_eoy, estimated_occupancy_l365d,  estimated_revenue_l365d,
		CASE 
			WHEN minimum_nights <= 6 THEN 'Short stay'
			WHEN minimum_nights <= 27 THEN 'Medium Stay'
			WHEN minimum_nights <= 45 THEN 'Monthly stay'
			WHEN minimum_nights >= 46 THEN 'Extended stay'
		ELSE NULL
		END AS stay_policy,
	
		first_review, last_review, number_of_reviews, number_of_reviews_ltm, number_of_reviews_l30d, number_of_reviews_ly,
		CASE 
			WHEN number_of_reviews_l30d >= 1 THEN 'Recently Reviewed'
			WHEN number_of_reviews_ltm >= 1 THEN 'Reviewed in Last Year'
			WHEN number_of_reviews >= 1 THEN 'Historically Reviewed'
			WHEN number_of_reviews = 0 THEN 'Never Reviewed'
		END AS listing_activity_status,
	
		review_scores_rating, review_scores_accuracy, review_scores_communication, review_scores_location, review_scores_value, reviews_per_month
FROM 'detailed_listings.csv'
),

room_type_price_quartiles AS (
	SELECT 
		room_type,
		QUANTILE_CONT(cleaned_price, 0.25) AS q1,
		QUANTILE_CONT(cleaned_price, 0.75) AS q3,
		QUANTILE_CONT(cleaned_price, 0.75) - QUANTILE_CONT(cleaned_price, 0.25) AS iqr
	FROM base_listings
	WHERE cleaned_price IS NOT NULL
	GROUP BY room_type
),

room_type_price_stats AS (
	SELECT 
		room_type,
		q1,
		q3,
		iqr,
		q1 - (1.5 * iqr) AS lower_bound,
		q3 + (1.5 * iqr) AS upper_bound
	FROM room_type_price_quartiles
),

cleaned_listings AS (
	SELECT 
		b.*,
		CASE 
			WHEN b.cleaned_price IS NULL THEN 'Missing price'
			WHEN b.cleaned_price < p.lower_bound THEN 'Low price outlier'
			WHEN b.cleaned_price > p.upper_bound THEN 'High price outlier'
			ELSE 'Typical range'
		END AS price_status
	FROM base_listings AS b
	LEFT JOIN room_type_price_stats AS p
		ON b.room_type = p.room_type
),
	
cleaned_calendar AS (
	SELECT 
		c.listing_id,	
		CAST(c.date AS DATE) AS date,
		c.available,
		c.minimum_nights,
		c.maximum_nights,
		YEAR(c.date) AS year,
		MONTH(c.date) AS month,
		CAST(DATE_TRUNC('month', c.date) AS DATE) AS year_month
	FROM 'detailed_calendar.csv' AS c
	INNER JOIN cleaned_listings AS l
		ON c.listing_id = l.id
),

cleaned_reviews AS (
	SELECT 
		r.listing_id,
		r.id AS review_id,
		CAST(r.date AS DATE) AS date,
		r.reviewer_id,
		r.reviewer_name,
		r.comments,
		YEAR(r.date) AS year,
		MONTH(r.date) AS month,
		CAST(DATE_TRUNC('month', r.date) AS DATE) AS year_month
	FROM 'detailed_reviews.csv' AS r
	INNER JOIN cleaned_listings AS l
		ON r.listing_id = l.id
)

SELECT 
	COUNT(*) AS total_neighbourhoods,
	COUNT(neighbourhood_group) AS non_null_neighbourhood_groups,
	COUNT(DISTINCT neighbourhood) AS distinct_neighbourhoods
FROM 'neighbourhoods.csv';

,total_neighbourhoods,non_null_neighbourhood_groups,distinct_neighbourhoods
0,78,0,78


Data Dictionary: https://docs.google.com/spreadsheets/d/1iWCNJcSutYqpULSQHlNyGInUvHg2BoUGoNRIGa6Szc4/edit?usp=sharing

# Screenshots (Hidden to Save Space)

![image-2](image-2.png)

![image-3](image-3.png)


![image-4](image-4.png)


![image-5](image-5.png)

![image-6](image-6.png)


![image-7](image-7.png)


![image-8](image-8.png)


![image-9](image-9.png)


**Denver Airbnb Analysis - Project Notes (Introduction and Data Profiling):**

- Calendar table grain: One record appears to represent one listing on one calendar date.
  
- Potential calendar key: (listing_id, date).
  
- Review table grain: One record appears to represent one individual review.
  
- Potential review key: id.
  
- Potential relationship: reviews.listing_id → listings.id.
  
- Important limitation: Calendar availability cannot automatically be interpreted as confirmed occupancy.

- id is Airbnb's unique identifier for a listing, while host_id identifies the host.

- neighbourhood_cleansed is calculated by geocoding each listing's latitude/longitude against public/open neighborhood boundaries, making it the better standardized geography field for our neighborhood analysis.

- price is the daily price in local currency, and the $ symbol is an export artifact. That will matter when we clean/cast the field for SQL analysis.

- availability_365 measures days marked available over the next 365 days, but Inside Airbnb explicitly warns that unavailable dates can mean either guest-booked or host-blocked. That confirms why we shouldn't call 365 - availability_365 "occupied nights."

- calculated_host_listings_count is specifically the number of that host's listings found in the current scrape within the city/region, which makes it more useful for our Denver market-concentration analysis than host_total_listings_count, whose calculation Airbnb does not disclose.

- reviews_per_month is an Inside Airbnb calculated field representing average monthly reviews over the listing's lifetime, and the dictionary even documents its approximate calculation.

--------

- There are 10 more distinct listing IDs represented in the calendar than there are listings in detailed_listings.csv.

- Every listing id has exactly 365 rows each in detailed_calendar

- Finding: 10 listing IDs represented in the detailed calendar are absent from the detailed listings snapshot.

- Referential integrity: The detailed reviews table contains 95 historical reviews associated with 8 listing IDs that are not present in the current listings snapshot. Additionally, 638 current listings have no records in the detailed reviews table.

- Issue: price is stored as text and contains currency symbols.
Treatment: Remove the currency formatting and convert the field to a numeric datatype before performing price calculations.

- Price is strongly right-skewed. A global IQR cutoff over-flags listings because room types have different price structures. Room-type-specific IQR is a better screening method, but flagged values should not be removed automatically because many may be legitimate high-end listings.

- Roughly 300 of the 4,251 priced listings are being flagged as statistical upper outliers. That’s about 7% of priced listings, which is plausible for a heavily right-skewed market.

- The biggest finding is the difference between the average ($276.04) and median ($176.45). The mean is much higher, which is strong evidence that the price distribution is right-skewed: a relatively small number of very expensive listings are pulling the average upward.

- From an analysis perspective, however, it's extremely important. Denver's Airbnb supply in this dataset is overwhelmingly entire homes/apartments: 85.71%. That tells us room_type should probably become one of our major segmentation dimensions throughout the project.

detailed_listings
- Grain: One row per listing
- Primary key candidate: id
- Uniqueness: Confirmed in current dataset
- NULLs in key: None

room_type and property_type
- 100% complete with four standardized categories. Entire home/apartment listings dominate the Denver dataset (85.71%), followed by private rooms (12.78%). No cleaning required. Retain as a key categorical segmentation variable.
- room_type answers "How much of the property does the guest get?", while property_type gives a more specific description of "What kind of accommodation/property is it?"
- "property_type contained 38 categories with substantial class imbalance. Inspection indicated that rare categories represented legitimate accommodation types rather than obvious data-quality errors. The original field was therefore retained, with broader analytical groupings considered for segment-level analysis."
- Entire home/apt - Entire home has the most listings at 1589 listings and 32.17% share. 
- I'm noticing there are private room types that could be better classified in 'Hotel room', including room in hotel, ...aparthotel, ...boutique hotel, ...hostel.
----------
- room_type: Low-cardinality broad classification with four complete, standardized categories. Useful for high-level market segmentation.
- property_type: Higher-cardinality field with 38 legitimate accommodation categories and a long-tailed distribution. Provides additional structural detail within each room type. Retain the raw field; broader derived categories may be created later if needed for analysis.
- room_type and property_type are complementary rather than redundant. room_type provides a broad classification of the rental arrangement, while property_type provides more granular information about the physical accommodation. Therefore, both fields should be retained.

Data-Cleaning for price 
- Issue: price is stored as text and contains currency symbols.
- Treatment: Remove the currency formatting and convert the field to a numeric datatype before performing price calculations. New column: cleaned_price

Listing counts for price thresholds
- $500–$999.99: 336 listings
- $1,000–$1,999.99: 53 listings
- $2,000+: 9 listings

Errors, Extreme Values, and Outliers 
- Data error — a value is demonstrably incorrect or unusable.
- Extreme value — a legitimate but unusually large/small observation.
- Statistical outlier — a value falling outside a defined statistical criterion such as 1.5×IQR.

------------

neighbourhood_cleansed
- no missing values
- 77 legitimate categories
- no apparent capitalization/whitespace duplication
- meaningful variation in listing counts
- strong analytical relevance
- compatible with our later geographic analysis
- neighbourhoods.csv contains 78 Denver neighborhoods. All 77 neighborhoods represented in the current listings snapshot match the reference table. Sun Valley is present in the neighborhood reference data but has no listings in the current detailed_listings.csv snapshot.

------------

accommodates
- accommodates contains no null or zero values and ranges from 1–16 guests. Listings at the upper bound appear consistent with large-group properties based on bedroom, bathroom, and listing-description information.
- There's another important consideration: 16 appears repeatedly. You may eventually discover that 16 is effectively a platform/category ceiling rather than the exact physical maximum occupancy of every property. For this project, however, you don't need to resolve that yet. Just don't interpret 16 as necessarily meaning "this property can accommodate exactly 16 and no more."

----------

bathrooms and bathrooms_text
- bathrooms_text reliably represents bathroom count and provides bathroom information for many listings where the numeric bathrooms field is missing. Among records where both fields are populated, the numeric values are consistent except for one identified discrepancy.
- When both fields are populated, bathrooms and the numeric bathroom count represented by bathrooms_text are highly consistent. One conflicting record was identified (bathrooms = 2, bathrooms_text = '3.5 baths'). This supports using bathrooms_text as a fallback source for missing numeric bathroom counts, subject to explicit handling of special text values.
- bathrooms_text is the more complete bathroom field. It contains usable bathroom information for 885 of the 887 records where numeric bathrooms is missing. Conversely, only 4 records have a numeric bathrooms value while bathrooms_text is missing. When both fields are populated, the values are highly consistent aside from one identified discrepancy.

----------

bedrooms/beds
- bedrooms and beds exhibit partially overlapping missingness. Approximately 75.6% of listings have both fields populated, while only 1.4% are missing both. Because each field is available for hundreds of records where the other is missing, both should be retained rather than treated as substitutes.
- One listing contains an unusually inconsistent capacity profile: 15 bedrooms, 50 beds, but an accommodates value of only 2. Because several capacity fields conflict, the record is flagged as a potential data-quality anomaly rather than automatically corrected or removed.
- For the eventual analysis, I would treat accommodates as your primary capacity variable, with bedrooms and beds as supplementary property characteristics. It's complete and directly represents the listing's stated guest capacity.

---------

minimum_nights
- Minimum-stay requirements are highly concentrated at a small number of values. One-night stays are the most common requirement (27.1%), while 29- and 30-night minimums collectively account for approximately 46.9% of listings. This suggests a substantial segment of the Denver Airbnb market is oriented toward longer stays. Extreme minimum-stay values also exist, reaching 500 nights, but these represent atypical listings and should not be interpreted as representative of the market.
- Minimum-stay policies show a highly polarized distribution. Approximately 46.9% of listings require 29–30 nights, while approximately 49.8% allow stays of six nights or fewer. Listings with minimum stays between 7 and 28 nights are comparatively rare at less than 1%.

----------

availability
- Inside Airbnb's available calendar status doesn't tell us why a date is unavailable. A host may have blocked dates, stopped accepting reservations temporarily, restricted the calendar, or the date may actually be booked.
- Calendar availability is substantially lower in the near term. Listings average approximately 30% availability over the next 30 days, compared with roughly 50–62% across subsequent future periods. This pattern may reflect a combination of reservations, host calendar restrictions, and other availability settings and should not be interpreted directly as occupancy.
- Availability fields were complete and remained within their expected bounds (0–30, 0–60, 0–90, and 0–365). Availability was substantially lower in the immediate 30-day window than in later future periods. Zero availability was particularly common over the next 30 days (35.1%), declining as the observation window expanded. Because unavailable calendar dates may represent bookings or host-imposed restrictions, availability is treated as a calendar-availability measure rather than an occupancy measure.
- The cumulative availability fields are logically consistent across the dataset. No listing has a shorter-window availability value greater than a longer-window availability value.

--------

- 638 listings have zero lifetime reviews, and exactly 638 listings have NULL reviews_per_month.
- reviews_per_month is NULL precisely for listings with no reviews rather than representing missing data in the conventional sense.
- For lifetime reviews, the middle 50% is roughly 3–85 reviews, yet the maximum reaches 1,798. Your earlier mean of 71.81 versus median of 21 reinforces the strong right skew.
- The LTM variable shows the same general phenomenon, although less extreme: 25% of listings received no reviews at all in the previous 12 months, while the upper 10% had at least roughly 38.
- This also tells us that when we eventually compare neighborhoods, median review activity may often be more representative than average review activity.
- Most Denver listings show some recent review activity, with approximately 72% recording at least one review during the previous 12 months. However, only about 43% recorded a review during the previous 30 days. Approximately 15% have historical reviews but none within the past year, while roughly 13% have never been reviewed.

number_of_reviews
- The mean being more than 3× the median, plus the 1,798 maximum, strongly suggests a right-skewed distribution. A relatively small number of highly reviewed listings are pulling the average upward.
- 638 listings have 0 lifetime reviews → about 12.9%

number_of_reviews_ltm
- That zero count is analytically interesting. A listing can have historical reviews but no recent reviews, which could indicate lower recent review activity, a listing that isn't currently operating much, or other factors. We shouldn't automatically call that "low demand."
- 1,365 listings have 0 reviews in the last 12 months → about 27.6%

number_of_reviews_l30d
- 2,803 listings have 0 reviews in the last 30 days → about 56.8%
- Finding: Recent review activity is highly concentrated. 56.8% of Denver listings recorded no reviews during the previous 30 days, resulting in a median of 0 despite a mean of 1.23 reviews per listing.

reviews_per_month
- is NULL precisely for listings with no reviews rather than representing missing data in the conventional sense.
- reviews_per_month contains 638 NULL values, all corresponding exactly to listings with zero lifetime reviews. These NULLs represent listings for which a monthly review rate has not been established rather than apparent data-quality errors.

---------

ratings
- Across all seven rating fields, you have 4,301 non-null values and 638 NULL values. That is especially notable because you previously found exactly 638 listings with number_of_reviews = 0.
- Your final query also found zero listings where number_of_reviews >= 1 while all seven review-score fields were NULL. So the evidence strongly suggests that the rating NULLs are structural: listings with no reviews do not have ratings.
- Ratings are extremely concentrated near 5.0. Every rating category has a median above 4.85, and most have Q3 = 5. This means these variables have a strong ceiling effect. A 4.7 rating might sound excellent in isolation, but within this particular market it could actually be relatively weak.
- Second, communication and check-in appear strongest. Their averages are 4.91 and 4.92 and medians are 4.98 and 4.97. Hosts generally seem to receive exceptionally high scores on these dimensions.
- Third, value stands out as the weakest dimension. Its mean of 4.79, median of 4.86 and Q1 of 4.74 are all noticeably below the other categories. That's potentially meaningful for our eventual pricing analysis: we may want to investigate whether higher-priced listings receive lower review_scores_value.
- Fourth, location is also somewhat lower than operational categories such as communication and check-in. That's interesting because location is largely a property characteristic rather than something a host can improve operationally.
- Listings with zero reviews have NULL review scores, while listings with at least one review have values for all seven review-score fields.
- Review-score fields contain 638 NULL values, corresponding exactly to listings with zero reviews. These NULLs represent unrated listings rather than erroneous missing data and will therefore be retained.

----------

host 
- Single-listing hosts make up 83.91% of all hosts, but account for only 56.37% of Denver's Airbnb listings.
- Hosts with more than 10 listings represent only 0.96% of hosts, yet control 15.02% of the listings in this dataset.
- 83.91% of hosts have exactly one listing, accounting for 56.37% of listings.
- 16.09% of hosts have multiple listings, accounting for 43.63% of listings.
- Hosts with more than 10 listings are only 0.96% of hosts, but account for 15.02% of listings.
- The 10 largest individual hosts account for 7.41% of all listings.
- Pricing: Superhost listings have a median asking price of $206 versus $135.82, roughly 52% higher. The average is also substantially higher ($323.77 vs. $212.46). Because both groups have averages substantially above their medians, that's another indication that price is right-skewed and reinforces our decision to pay attention to medians.
- Review activity: Superhost listings average 2.09 reviews/month versus 1.15 for non-Superhosts. That's a more useful comparison than the raw total-review numbers because there are different numbers of listings in each group.
- Large-host presence varies substantially across Denver neighborhoods. Some neighborhoods have relatively high shares of listings operated by hosts with portfolios exceeding 10 Denver listings.
- Validated calculated_host_listings_count against an independently calculated COUNT(*) by host_id. No discrepancies were identified among the 4,939 Denver listings, indicating that the field accurately represents the number of listings associated with each host within this dataset.

--------

estimated occupancy and revenue 
- Estimated Occupancy: Complete across all 4,939 listings, ranging from 0–255 estimated occupied nights. The median is 70 nights versus a mean of 103.91, indicating a right-skewed distribution. 1,365 listings (27.6%) have zero estimated occupancy. No negative or >365 values were identified.
- Estimated Revenue: Available for 4,251 listings and missing for 688. Median estimated annual revenue is $15,979 compared with a mean of $28,047.32, indicating substantial right skew from high-revenue listings. The maximum is $3,795,253.
- Revenue Nulls: All 688 missing estimated-revenue values correspond exactly to listings with missing prices. No listing with a populated price has missing estimated revenue.
- Metric Dependency: For all comparable records, estimated_revenue_l365d equals price × estimated_occupancy_l365d. Estimated revenue should therefore be treated as a derived estimate, not an independently observed measure of actual Airbnb revenue.

## detailed_calendar.csv

- Grain: one listing-calendar-date per row
- Composite key: (listing_id, date)
- detailed_calendar.csv grain and key: The dataset contains 1,806,385 rows representing 4,949 distinct listings. Each listing has exactly 365 records corresponding to 365 distinct dates. No duplicate (listing_id, date) combinations or NULL values in either key field were identified. Therefore, one row represents one listing on one calendar date, and (listing_id, date) is validated as the composite primary key.
- Cross-dataset integrity: detailed_calendar.csv contains 4,949 listing IDs compared with 4,939 listings in detailed_listings.csv, indicating 10 calendar listing IDs are absent from the current listings snapshot.
- 4,305 listings (87.0%) cover June 30, 2026 → June 29, 2027.
- 644 listings (13.0%) cover July 2, 2026 → July 1, 2027.
- Calendar date coverage: Each of the 4,949 listings contains exactly 365 unique calendar dates, but listings do not all share the same calendar window. 4,305 listings (87.0%) span June 30, 2026 through June 29, 2027, while 644 listings (13.0%) span July 2, 2026 through July 1, 2027. This suggests the calendar records were captured across different scrape dates/batches. Date-level analyses should account for differences in listing coverage near the boundaries of the dataset.

----------

availability
- Availability: The available field is complete and contains only the expected Boolean values. Across all 1,806,385 listing-date records, 1,021,669 (56.56%) are marked available and 784,716 (43.44%) are marked unavailable.
- False means the date is not available on the Airbnb calendar, but we don't know whether that's because it was booked, host-blocked, restricted, or unavailable for some other reason.
- Listing-level calendar availability: Availability varies substantially across Denver listings. The median listing is marked available for 236 of its 365 calendar dates (64.7%), compared with a mean of 206.44 days (56.6%). Approximately 40.9% of listings are available for at least 271 days, while 7.7% have zero available dates. These differences demonstrate substantial variation in calendar availability across listings. Because unavailable dates may represent either reservations or host-imposed restrictions, these values should not be interpreted directly as occupancy.
- Cross-dataset availability validation: Calendar-derived annual availability was compared with detailed_listings.availability_365 for all 4,939 listings represented in both datasets. 4,938 listings (99.98%) matched exactly. One listing was inconsistent: availability_365 reported 0 available days, while its 365 calendar records contained 207 available and 158 unavailable dates. The calendar record itself contained a complete 365-day window and plausible variation in availability over time. Because the source of the discrepancy cannot be determined from the available data, the record is retained and documented as a cross-dataset inconsistency rather than corrected.
- Calendar availability is substantially lower in the immediate future, rises considerably farther into the booking window, peaks around November–December in this snapshot, and then declines somewhat in later spring/summer months.

------------

minimum and maximum nights
- Minimum-stay requirements are considerably more dynamic than maximum-stay requirements. Approximately 24.5% of listings have multiple minimum-night requirements across their 365-day calendar, compared with only about 2.5% having multiple maximum-night requirements.
- That makes intuitive analytical sense as something worth investigating: hosts may configure different minimum stays for different dates. We don't need to determine why yet.
- Calendar stay requirements: minimum_nights and maximum_nights are complete across all 1,806,385 calendar records. Calendar-level minimum stays range from 1–500 nights, while maximum stays range from 1–1,125 nights. Stay requirements are not necessarily constant within a listing's calendar. Of 4,949 listings, 1,213 (24.5%) have multiple minimum-night requirements across their 365 dates, while 125 (2.5%) have multiple maximum-night requirements. Minimum-stay restrictions therefore exhibit substantially greater date-level variation than maximum-stay restrictions.
- The listing-level stay-restriction values are highly consistent with calendar-level restrictions, but calendar data contains additional date-specific variation that the listing-level fields do not capture.
- - Cross-dataset stay-restriction validation: Listing-level minimum_nights and maximum_nights were compared against all calendar-level values for each listing. Among 4,939 listings represented in both datasets, 4,938 (99.98%) had a listing-level minimum-night value occurring on at least one calendar date, and 4,938 (99.98%) had a listing-level maximum-night value occurring on at least one calendar date. Calendar-level restrictions can vary by date, particularly minimum stays, so listing-level fields should not be interpreted as necessarily applying uniformly across the entire 365-day calendar.
- Cross-dataset anomaly: One listing was identified as the sole exception across multiple listing-to-calendar validation tests. Its listing-level record reports minimum_nights = 0, maximum_nights = 0, and availability_365 = 0, while its calendar contains a complete 365-day window with minimum_nights = 1, maximum_nights = 365, and 207 available dates. The remaining 4,938 listings shared by both datasets reconcile successfully across these checks. Because the cause of the discrepancy cannot be established from the source data, the listing should be flagged as an anomalous cross-dataset record rather than automatically corrected.
- Stay-restriction consistency: 3,608 of 1,806,385 calendar records (~0.20%) have minimum_nights > maximum_nights. These records are highly concentrated, affecting only 14 of 4,949 listings (~0.28%). The condition appears logically inconsistent under a straightforward interpretation of minimum- and maximum-stay restrictions, but the records are not automatically classified as source errors because the underlying Airbnb rule semantics may be more complex. The affected listings were flagged for further inspection rather than corrected or removed.
- Calendar stay-rule consistency: 3,608 calendar records (~0.20%) have minimum_nights > maximum_nights, affecting 14 of 4,949 calendar listings (~0.28%). The condition is highly concentrated: 11 listings account for nearly all affected records, with 270–365 affected dates each, while three listings are affected on only one date. Most heavily affected listings have a constant 29-night minimum while their maximum-night restriction varies by date. Because the underlying Airbnb booking-rule semantics cannot be fully determined from the source data, these records are retained and flagged rather than automatically classified as errors or corrected.

## detailed_reviews.csv

- detailed_reviews grain/key: One row represents one individual Airbnb review. id is a valid primary-key candidate in the current dataset: all 354,741 review IDs are non-NULL and unique.
- Reviews/listings relationship: detailed_reviews.listing_id relates reviews to detailed_listings.id. Of 354,741 review records, 95 historical reviews reference 8 listing IDs that are absent from the current listings snapshot. Conversely, 638 current listings have no records in the detailed reviews table. The unmatched historical reviews are retained because the reviews dataset spans many years and may include listings no longer represented in the current snapshot.
- Review-count reconciliation: For all 4,939 current listings, detailed_listings.number_of_reviews exactly equals the number of corresponding records in detailed_reviews.csv. This includes the 638 listings reporting zero lifetime reviews, confirming that their absence from detailed_reviews is consistent with the listing-level review count rather than apparent missing review data.
- Reviewer-field completeness: All 354,741 review records contain both a reviewer_id and reviewer_name. No records contain a reviewer ID without a name or a name without an ID. Reviewer-level analysis should use reviewer_id rather than reviewer_name as the identifier.
- For every listing included by the INNER JOIN, the listing table's first_review and last_review fields exactly agree with the minimum and maximum dates observed in detailed_reviews.csv.